## **save the coconut.sdf file inside coconut_analysis in 1_input_data**

first of all copy and paste the sdf file downloaded from coconut into the folder 1_input_data

### CREATE COCONUT ANALYSIS DIRECTORY STRUCTURE

In [1]:
# ============================================================================
# CREATE COCONUT ANALYSIS DIRECTORY STRUCTURE
# ============================================================================

import os

COCONUT_DIR = "coconut_analysis"

folders = [
    "1_input_data",
    "2_models/Morgan",
    "2_models/MACCS",
    "3_filtering",
    "4_morgan_screening",
    "4_maccs_screening",
    "5_final_candidates"
]

for folder in folders:
    path = os.path.join(COCONUT_DIR, folder)
    os.makedirs(path, exist_ok=True)

print("=" * 80)
print("COCONUT ANALYSIS DIRECTORY CREATED")
print("=" * 80)

for folder in folders:
    print(os.path.join(COCONUT_DIR, folder))

COCONUT ANALYSIS DIRECTORY CREATED
coconut_analysis/1_input_data
coconut_analysis/2_models/Morgan
coconut_analysis/2_models/MACCS
coconut_analysis/3_filtering
coconut_analysis/4_morgan_screening
coconut_analysis/4_maccs_screening
coconut_analysis/5_final_candidates


In [ ]:
# ============================================================================
# CHECK COCONUT ANALYSIS DIRECTORY STRUCTURE AND INPUT SDF
# ============================================================================

import os

COCONUT_DIR = "coconut_analysis"

expected_paths = {
    "Main folder":
        COCONUT_DIR,

    "Input data folder":
        os.path.join(COCONUT_DIR, "1_input_data"),

    "Morgan models folder":
        os.path.join(COCONUT_DIR, "2_models", "Morgan"),

    "MACCS models folder":
        os.path.join(COCONUT_DIR, "2_models", "MACCS"),

    "Filtering folder":
        os.path.join(COCONUT_DIR, "3_filtering"),

    "Morgan screening folder":
        os.path.join(COCONUT_DIR, "4_morgan_screening"),

    "MACCS screening folder":
        os.path.join(COCONUT_DIR, "4_maccs_screening"),

    "Final candidates folder":
        os.path.join(COCONUT_DIR, "5_final_candidates"),

    "COCONUT SDF":
        os.path.join(
            COCONUT_DIR,
            "1_input_data",
            "coconut_sdf_3d-09-2026.sdf"
        )
}


print("=" * 90)
print("COCONUT ANALYSIS DIRECTORY CHECK")
print("=" * 90)

all_ok = True

for name, path in expected_paths.items():

    if os.path.exists(path):

        if os.path.isfile(path):
            size_gb = os.path.getsize(path) / (1024 ** 3)
            print(f"✓ {name:<30} : FOUND")
            print(f"  Path: {os.path.abspath(path)}")
            print(f"  Size: {size_gb:.2f} GB")

        else:
            print(f"✓ {name:<30} : FOUND")
            print(f"  Path: {os.path.abspath(path)}")

    else:
        print(f"✗ {name:<30} : NOT FOUND")
        print(f"  Expected: {os.path.abspath(path)}")
        all_ok = False


print("\n" + "=" * 90)

if all_ok:
    print("✓ ALL CHECKS PASSED")
    print("✓ COCONUT SDF is correctly placed in 1_input_data/")
    print("✓ Directory structure is ready for the next step.")
else:
    print("⚠ SOME CHECKS FAILED")
    print("Please check the missing folder/file shown above.")

print("=" * 90)

COCONUT ANALYSIS DIRECTORY CHECK
✓ Main folder                    : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis
✓ Input data folder              : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/1_input_data
✓ Morgan models folder           : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/2_models/Morgan
✓ MACCS models folder            : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/2_models/MACCS
✓ Filtering folder               : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/3_filtering
✓ Morgan screening folder        : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/4_morgan_screening
✓ MACCS screening folder         : FOUND
  Path: /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/4_maccs_screening
✓ Final candidates f

In [3]:
!cp grand_final_selection/final_morgan_model.joblib \
coconut_analysis/2_models/Morgan/final_morgan_model.joblib

!cp grand_final_selection/final_maccs_model.joblib \
coconut_analysis/2_models/MACCS/final_maccs_model.joblib

In [4]:
# ============================================================================
# COCONUT DATABASE FILTERING
# DUPLICATE + NP-LIKENESS + PAINS + BRENK + LIPINSKI FILTER
# ============================================================================


# ============================================================================
# 1. IMPORT LIBRARIES
# ============================================================================

import os
import warnings
import numpy as np
import pandas as pd

from rdkit import Chem
from rdkit.Chem import FilterCatalog
from rdkit.Chem import Descriptors

# RDKit Native Natural Product Scorer module (if available in your build)
try:
    from rdkit.Chem.rdNPScore import scoreNP
except ImportError:
    scoreNP = None

warnings.filterwarnings("ignore")


# ============================================================================
# 2. SETTINGS
# ============================================================================

# Main COCONUT analysis directory
COCONUT_DIR = "coconut_analysis"

# --------------------------------------------------------------------------
# INPUT
# Original COCONUT SDF
# --------------------------------------------------------------------------

INPUT_SDF = os.path.join(
    COCONUT_DIR,
    "1_input_data",
    "coconut_sdf_3d-08-2026.sdf"
)

# --------------------------------------------------------------------------
# OUTPUT
# Filtered COCONUT SDF
# --------------------------------------------------------------------------

FILTERING_DIR = os.path.join(
    COCONUT_DIR,
    "3_filtering"
)

# Make sure the filtering directory exists
os.makedirs(FILTERING_DIR, exist_ok=True)

OUTPUT_SDF = os.path.join(
    FILTERING_DIR,
    "coconut_filtered.sdf"
)

# --------------------------------------------------------------------------
# FILTER SETTINGS
# --------------------------------------------------------------------------

# Keep compounds with NP score > 0.0
MIN_NP_LIKENESS_SCORE = 0.0

# Maximum allowed Lipinski violations
# 1 = allow up to one violation
# 0 = strict Rule of 5
MAX_LIPINSKI_VIOLATIONS = 1


# ============================================================================
# 3. CHECK INPUT FILE
# ============================================================================

if not os.path.exists(INPUT_SDF):
    raise FileNotFoundError(
        f"\nInput COCONUT SDF file not found:\n"
        f"{os.path.abspath(INPUT_SDF)}"
    )

print("=" * 90)
print("COCONUT DATABASE FILTERING")
print("=" * 90)

print(f"Input file              : {os.path.abspath(INPUT_SDF)}")
print(f"Output file             : {os.path.abspath(OUTPUT_SDF)}")
print(f"NP-Likeness threshold   : > {MIN_NP_LIKENESS_SCORE}")
print(f"Max Lipinski violations : {MAX_LIPINSKI_VIOLATIONS}")

print("=" * 90)


# ============================================================================
# 4. CREATE PAINS & BRENK FILTERS
# ============================================================================

# --------------------------------------------------------------------------
# PAINS Filter
# --------------------------------------------------------------------------

pains_params = FilterCatalog.FilterCatalogParams()

pains_params.AddCatalog(
    FilterCatalog.FilterCatalogParams.FilterCatalogs.PAINS
)

pains_catalog = FilterCatalog.FilterCatalog(
    pains_params
)


# --------------------------------------------------------------------------
# BRENK Filter
# --------------------------------------------------------------------------

brenk_params = FilterCatalog.FilterCatalogParams()

brenk_params.AddCatalog(
    FilterCatalog.FilterCatalogParams.FilterCatalogs.BRENK
)

brenk_catalog = FilterCatalog.FilterCatalog(
    brenk_params
)


# ============================================================================
# 5. HELPER FUNCTION: NP-LIKENESS SCORE
# ============================================================================

def get_np_likeness_score(mol):
    """
    Retrieves NP-Likeness score from SDF properties/tags if present,
    or calculates via scoreNP if available.

    Returns:
        float : NP-Likeness score
        None  : if no score is available
    """

    # ----------------------------------------------------------------------
    # 1. Check common SDF property/tag names
    # ----------------------------------------------------------------------

    for prop in [
        "NP_LIKENESS_score",
        "NP_LIKENESS",
        "np_score",
        "npl_score",
        "natural_product_likeness",
        "natural_product_likeness_score",
        "coconut_np_score",
        "NP_SCORE"
    ]:

        if mol.HasProp(prop):

            try:
                return float(
                    mol.GetProp(prop)
                )

            except ValueError:
                pass


    # ----------------------------------------------------------------------
    # 2. Calculate dynamically if rdNPScore is available
    # ----------------------------------------------------------------------

    if scoreNP is not None:

        try:
            return scoreNP(mol)

        except Exception:
            pass


    # ----------------------------------------------------------------------
    # 3. No NP score available
    # ----------------------------------------------------------------------

    return None


# ============================================================================
# 6. HELPER FUNCTION: LIPINSKI FILTER
# ============================================================================

def passes_lipinski(mol, max_violations=1):
    """
    Checks Lipinski Rule of 5:

    Molecular Weight <= 500 Da
    LogP <= 5
    H-Bond Donors <= 5
    H-Bond Acceptors <= 10

    Returns:
        True  -> molecule passes
        False -> molecule fails
    """

    mw = Descriptors.MolWt(mol)

    logp = Descriptors.MolLogP(mol)

    hbd = Descriptors.NumHDonors(mol)

    hba = Descriptors.NumHAcceptors(mol)


    violations = sum([
        mw > 500,
        logp > 5,
        hbd > 5,
        hba > 10
    ])


    return violations <= max_violations


# ============================================================================
# 7. READ COCONUT SDF & CREATE WRITER
# ============================================================================

supplier = Chem.SDMolSupplier(
    INPUT_SDF,
    removeHs=False,
    sanitize=True
)

writer = Chem.SDWriter(
    OUTPUT_SDF
)


# ============================================================================
# 8. COUNTERS & TRACKING
# ============================================================================

total_records = 0

invalid_molecules = 0

duplicate_molecules = 0

low_np_score_molecules = 0

pains_molecules = 0

brenk_molecules = 0

lipinski_molecules = 0

final_molecules = 0


# --------------------------------------------------------------------------
# Store canonical SMILES for duplicate detection
# --------------------------------------------------------------------------

seen_smiles = set()


# ============================================================================
# 9. PROCESS COCONUT MOLECULES
# ============================================================================

print("\nStarting filtering...\n")


for mol in supplier:

    total_records += 1


    # ----------------------------------------------------------------------
    # Progress display
    # ----------------------------------------------------------------------

    if total_records % 10000 == 0:

        print(
            f"Processed: {total_records:,} | "
            f"Final kept: {final_molecules:,} | "
            f"Duplicates: {duplicate_molecules:,} | "
            f"Low NP Score: {low_np_score_molecules:,} | "
            f"PAINS: {pains_molecules:,} | "
            f"BRENK: {brenk_molecules:,} | "
            f"Lipinski: {lipinski_molecules:,}"
        )


    # ======================================================================
    # 1. MOLECULE VALIDITY CHECK
    # ======================================================================

    if mol is None:

        invalid_molecules += 1

        continue


    # ======================================================================
    # 2. CANONICAL SMILES GENERATION
    # ======================================================================

    try:

        canonical_smiles = Chem.MolToSmiles(
            mol,
            canonical=True
        )

    except Exception:

        invalid_molecules += 1

        continue


    # ======================================================================
    # 3. DUPLICATE FILTER
    # ======================================================================

    if canonical_smiles in seen_smiles:

        duplicate_molecules += 1

        continue


    seen_smiles.add(
        canonical_smiles
    )


    # ======================================================================
    # 4. NP-LIKENESS FILTER
    # ======================================================================

    np_score = get_np_likeness_score(mol)


    # Only remove when:
    # - score exists
    # - score <= threshold

    if (
        np_score is not None
        and np_score <= MIN_NP_LIKENESS_SCORE
    ):

        low_np_score_molecules += 1

        continue


    # ======================================================================
    # 5. PAINS FILTER
    # ======================================================================

    if pains_catalog.HasMatch(mol):

        pains_molecules += 1

        continue


    # ======================================================================
    # 6. BRENK FILTER
    # ======================================================================

    if brenk_catalog.HasMatch(mol):

        brenk_molecules += 1

        continue


    # ======================================================================
    # 7. LIPINSKI FILTER
    # ======================================================================

    if not passes_lipinski(
        mol,
        max_violations=MAX_LIPINSKI_VIOLATIONS
    ):

        lipinski_molecules += 1

        continue


    # ======================================================================
    # 8. PASSED ALL FILTERS
    # ======================================================================

    writer.write(mol)

    final_molecules += 1


# ============================================================================
# 10. CLOSE OUTPUT WRITER
# ============================================================================

writer.close()


# ============================================================================
# 11. CALCULATE TOTAL REMOVED
# ============================================================================

total_removed = (
    invalid_molecules
    + duplicate_molecules
    + low_np_score_molecules
    + pains_molecules
    + brenk_molecules
    + lipinski_molecules
)


# ============================================================================
# 12. FINAL SUMMARY
# ============================================================================

print("\n")

print("=" * 90)
print("COCONUT FILTERING COMPLETED")
print("=" * 90)

print(
    f"Original SDF records        : "
    f"{total_records:,}"
)

print(
    f"Invalid/unreadable          : "
    f"{invalid_molecules:,}"
)

print(
    f"Duplicate molecules         : "
    f"{duplicate_molecules:,}"
)

print(
    f"Low NP score (<= "
    f"{MIN_NP_LIKENESS_SCORE:.1f})   : "
    f"{low_np_score_molecules:,}"
)

print(
    f"PAINS flagged               : "
    f"{pains_molecules:,}"
)

print(
    f"BRENK flagged               : "
    f"{brenk_molecules:,}"
)

print(
    f"Lipinski failed             : "
    f"{lipinski_molecules:,}"
)

print("-" * 90)

print(
    f"Total removed               : "
    f"{total_removed:,}"
)

print(
    f"Final filtered molecules    : "
    f"{final_molecules:,}"
)

print("=" * 90)


# ============================================================================
# 13. VERIFY FINAL COUNT
# ============================================================================

calculated_final = (
    total_records - total_removed
)

print(
    f"\nVerification calculated final : "
    f"{calculated_final:,}"
)

if calculated_final == final_molecules:

    print("✓ Verification PASSED")

else:

    print("⚠ Verification FAILED — check counters")


# ============================================================================
# 14. OUTPUT LOCATION
# ============================================================================

print("\nFiltered SDF saved as:")
print(os.path.abspath(OUTPUT_SDF))

print("\nCOCONUT filtering directory:")
print(os.path.abspath(FILTERING_DIR))

print("=" * 90)

<frozen importlib._bootstrap>:241: RuntimeWarning: to-Python converter for boost::shared_ptr<RDKit::FilterHierarchyMatcher> already registered; second conversion method ignored.
<frozen importlib._bootstrap>:241: RuntimeWarning: to-Python converter for boost::shared_ptr<RDKit::FilterCatalogEntry> already registered; second conversion method ignored.


COCONUT DATABASE FILTERING
Input file              : /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/1_input_data/coconut_sdf_3d-08-2026.sdf
Output file             : /data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/3_filtering/coconut_filtered.sdf
NP-Likeness threshold   : > 0.0
Max Lipinski violations : 1

Starting filtering...



[20:20:00] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 5 ignored


Processed: 10,000 | Final kept: 3,368 | Duplicates: 4 | Low NP Score: 0 | PAINS: 1,013 | BRENK: 5,302 | Lipinski: 312


[20:20:10] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 8 ignored
[20:20:14] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 52 ignored
[20:20:14] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 56 ignored
[20:20:20] Warning: ambiguous stereochemistry - overlapping neighbors  - at atom 26 ignored
[20:20:20] Warning: ambiguous stereochemistry - overlapping neighbors  - at atom 28 ignored


...

Processed: 700,000 | Final kept: 174,749 | Duplicates: 21,727 | Low NP Score: 0 | PAINS: 53,172 | BRENK: 420,807 | Lipinski: 29,544


[20:32:27] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 10 ignored
[20:32:28] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 6 ignored


Processed: 710,000 | Final kept: 177,795 | Duplicates: 22,222 | Low NP Score: 0 | PAINS: 53,863 | BRENK: 426,164 | Lipinski: 29,955


[20:32:33] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 5 ignored
[20:32:33] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 48 ignored
[20:32:35] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 11 ignored
[20:32:36] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 11 ignored
[20:32:38] Warning: ambiguous stereochemistry - zero final chiral volume - at atom 40 ignored


Processed: 720,000 | Final kept: 180,202 | Duplicates: 22,842 | Low NP Score: 0 | PAINS: 54,739 | BRENK: 431,704 | Lipinski: 30,512
Processed: 730,000 | Final kept: 182,379 | Duplicates: 23,573 | Low NP Score: 0 | PAINS: 55,409 | BRENK: 437,836 | Lipinski: 30,802


COCONUT FILTERING COMPLETED
Original SDF records        : 737,343
Invalid/unreadable          : 0
Duplicate molecules         : 24,148
Low NP score (<= 0.0)   : 0
PAINS flagged               : 56,115
BRENK flagged               : 443,378
Lipinski failed             : 30,962
------------------------------------------------------------------------------------------
Total removed               : 554,603
Final filtered molecules    : 182,740

Verification calculated final : 182,740
✓ Verification PASSED

Filtered SDF saved as:
/data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analysis/3_filtering/coconut_filtered.sdf

COCONUT filtering directory:
/data/research/rajesh_ghimire_ramechhap/final_rajesh_ml/coconut_analy

In [5]:
# ============================================================================
# 2. SETTINGS
# ============================================================================

import os

# ============================================================================
# MAIN PROJECT DIRECTORY
# ============================================================================

PROJECT_DIR = "coconut_analysis"


# ============================================================================
# INPUT SDF
# ============================================================================

SDF_FILE = os.path.join(
    PROJECT_DIR,
    "3_filtering",
    "coconut_filtered.sdf"
)


# ============================================================================
# FINAL TRAINED MODELS
# ============================================================================

MORGAN_MODEL_FILE = os.path.join(
    PROJECT_DIR,
    "2_models",
    "Morgan",
    "final_morgan_model.joblib"
)

MACCS_MODEL_FILE = os.path.join(
    PROJECT_DIR,
    "2_models",
    "MACCS",
    "final_maccs_model.joblib"
)


# ============================================================================
# OUTPUT DIRECTORIES
# ============================================================================

MORGAN_OUTPUT_DIR = os.path.join(
    PROJECT_DIR,
    "4_morgan_screening"
)

MACCS_OUTPUT_DIR = os.path.join(
    PROJECT_DIR,
    "4_maccs_screening"
)

FINAL_OUTPUT_DIR = os.path.join(
    PROJECT_DIR,
    "5_final_candidates"
)


# Create output directories if they do not exist
os.makedirs(MORGAN_OUTPUT_DIR, exist_ok=True)
os.makedirs(MACCS_OUTPUT_DIR, exist_ok=True)
os.makedirs(FINAL_OUTPUT_DIR, exist_ok=True)


# ============================================================================
# FINGERPRINT SETTINGS
# ============================================================================

MORGAN_RADIUS = 3
MORGAN_NBITS = 2048

MACCS_NBITS = 166


# ============================================================================
# CHECK PATHS
# ============================================================================

print("=" * 70)
print("COCONUT SCREENING SETTINGS")
print("=" * 70)

print(f"\nInput SDF:")
print(SDF_FILE)

print(f"\nMorgan model:")
print(MORGAN_MODEL_FILE)

print(f"\nMACCS model:")
print(MACCS_MODEL_FILE)

print(f"\nMorgan output:")
print(MORGAN_OUTPUT_DIR)

print(f"\nMACCS output:")
print(MACCS_OUTPUT_DIR)

print(f"\nFinal candidates:")
print(FINAL_OUTPUT_DIR)


# ============================================================================
# VERIFY REQUIRED INPUT FILES
# ============================================================================

print("\n" + "=" * 70)
print("PATH VERIFICATION")
print("=" * 70)

if not os.path.isfile(SDF_FILE):
    raise FileNotFoundError(
        f"Filtered SDF not found:\n{SDF_FILE}"
    )

if not os.path.isfile(MORGAN_MODEL_FILE):
    raise FileNotFoundError(
        f"Morgan model not found:\n{MORGAN_MODEL_FILE}"
    )

if not os.path.isfile(MACCS_MODEL_FILE):
    raise FileNotFoundError(
        f"MACCS model not found:\n{MACCS_MODEL_FILE}"
    )

print("✓ Filtered SDF found")
print("✓ Morgan model found")
print("✓ MACCS model found")
print("\nAll required input files are ready.")

COCONUT SCREENING SETTINGS

Input SDF:
coconut_analysis/3_filtering/coconut_filtered.sdf

Morgan model:
coconut_analysis/2_models/Morgan/final_morgan_model.joblib

MACCS model:
coconut_analysis/2_models/MACCS/final_maccs_model.joblib

Morgan output:
coconut_analysis/4_morgan_screening

MACCS output:
coconut_analysis/4_maccs_screening

Final candidates:
coconut_analysis/5_final_candidates

PATH VERIFICATION
✓ Filtered SDF found
✓ Morgan model found
✓ MACCS model found

All required input files are ready.


In [6]:
# ============================================================================
# 4. LOAD FINAL TRAINED MODELS
# ============================================================================

import joblib

print("\n" + "=" * 110)
print("LOADING FINAL TRAINED MODELS")
print("=" * 110)


# ============================================================================
# LOAD MORGAN MODEL
# ============================================================================

best_morgan_model = joblib.load(
    MORGAN_MODEL_FILE
)


# ============================================================================
# LOAD MACCS MODEL
# ============================================================================

best_maccs_model = joblib.load(
    MACCS_MODEL_FILE
)


# ============================================================================
# DISPLAY LOADED MODELS
# ============================================================================

print(
    f"\n✓ Morgan model loaded successfully:"
    f"\n  {MORGAN_MODEL_FILE}"
    f"\n  Model: {type(best_morgan_model).__name__}"
)

print(
    f"\n✓ MACCS model loaded successfully:"
    f"\n  {MACCS_MODEL_FILE}"
    f"\n  Model: {type(best_maccs_model).__name__}"
)


LOADING FINAL TRAINED MODELS

✓ Morgan model loaded successfully:
  coconut_analysis/2_models/Morgan/final_morgan_model.joblib
  Model: ExtraTreesClassifier

✓ MACCS model loaded successfully:
  coconut_analysis/2_models/MACCS/final_maccs_model.joblib
  Model: VotingClassifier


In [7]:
# ============================================================================
# 5. VERIFY MODEL CLASSES & CAPABILITIES
# ============================================================================

print("=" * 110)
print("MODEL CLASS & PREDICTION CAPABILITY VERIFICATION")
print("=" * 110)

if not hasattr(best_morgan_model, "classes_"):
    raise ValueError("Morgan model does not contain classes_.")

if not hasattr(best_maccs_model, "classes_"):
    raise ValueError("MACCS model does not contain classes_.")

print(
    f"\nMorgan classes: "
    f"{list(best_morgan_model.classes_)}"
)

print(
    f"MACCS classes: "
    f"{list(best_maccs_model.classes_)}"
)

for model_name, model in [
    ("Morgan", best_morgan_model),
    ("MACCS", best_maccs_model)
]:

    print(f"\n{model_name} model capabilities:")
    print(f"  predict()       : {hasattr(model, 'predict')}")
    print(f"  predict_proba() : {hasattr(model, 'predict_proba')}")

MODEL CLASS & PREDICTION CAPABILITY VERIFICATION

Morgan classes: [np.int64(0), np.int64(1)]
MACCS classes: [np.int64(0), np.int64(1)]

Morgan model capabilities:
  predict()       : True
  predict_proba() : True

MACCS model capabilities:
  predict()       : True
  predict_proba() : True


In [8]:
# ============================================================================
# 5. VERIFY MODEL FEATURE DIMENSIONS
# ============================================================================

print("\n" + "=" * 110)
print("MODEL FEATURE DIMENSION VERIFICATION")
print("=" * 110)

morgan_features = best_morgan_model.n_features_in_
maccs_features = best_maccs_model.n_features_in_

print(f"\nMorgan model expects : {morgan_features} features")
print(f"Expected Morgan     : {MORGAN_NBITS} features")

print(f"\nMACCS model expects  : {maccs_features} features")
print(f"Expected MACCS       : {MACCS_NBITS} features")


# ============================================================================
# VERIFY
# ============================================================================

if morgan_features != MORGAN_NBITS:
    raise ValueError(
        f"Morgan feature mismatch: model expects {morgan_features}, "
        f"but screening is configured for {MORGAN_NBITS}."
    )

if maccs_features != MACCS_NBITS:
    raise ValueError(
        f"MACCS feature mismatch: model expects {maccs_features}, "
        f"but screening is configured for {MACCS_NBITS}."
    )

print("\n✓ Morgan feature dimension verified")
print("✓ MACCS feature dimension verified")
print("\nAll model dimensions are correct.")


MODEL FEATURE DIMENSION VERIFICATION

Morgan model expects : 2048 features
Expected Morgan     : 2048 features

MACCS model expects  : 166 features
Expected MACCS       : 166 features

✓ Morgan feature dimension verified
✓ MACCS feature dimension verified

All model dimensions are correct.


In [9]:
# ============================================================================
# 7. FINAL PRE-SCREENING SUMMARY & READINESS CHECK
# ============================================================================

print("=" * 110)
print("FINAL PRE-SCREENING SUMMARY")
print("=" * 110)


# ============================================================================
# MORGAN
# ============================================================================

print(
    f"\nMorgan:"
    f"\n  Model              : {type(best_morgan_model).__name__}"
    f"\n  Fingerprint        : Morgan"
    f"\n  Radius             : {MORGAN_RADIUS}"
    f"\n  Number of bits     : {MORGAN_NBITS}"
    f"\n  Classes            : {list(best_morgan_model.classes_)}"
    f"\n  Features expected  : {best_morgan_model.n_features_in_}"
)


# ============================================================================
# MACCS
# ============================================================================

print(
    f"\nMACCS:"
    f"\n  Model              : {type(best_maccs_model).__name__}"
    f"\n  Fingerprint        : MACCS"
    f"\n  Number of keys     : {MACCS_NBITS}"
    f"\n  Classes            : {list(best_maccs_model.classes_)}"
    f"\n  Features expected  : {best_maccs_model.n_features_in_}"
)


# ============================================================================
# READINESS CHECKS
# ============================================================================

print("\n" + "=" * 110)
print("SCREENING READINESS")
print("=" * 110)

checks = {
    "Filtered COCONUT SDF exists":
        os.path.isfile(SDF_FILE),

    "Morgan model exists":
        os.path.isfile(MORGAN_MODEL_FILE),

    "MACCS model exists":
        os.path.isfile(MACCS_MODEL_FILE),

    "Morgan model loaded":
        best_morgan_model is not None,

    "MACCS model loaded":
        best_maccs_model is not None,

    "Morgan has predict()":
        hasattr(best_morgan_model, "predict"),

    "Morgan has predict_proba()":
        hasattr(best_morgan_model, "predict_proba"),

    "MACCS has predict()":
        hasattr(best_maccs_model, "predict"),

    "MACCS has predict_proba()":
        hasattr(best_maccs_model, "predict_proba"),

    "Morgan expects 2048 features":
        best_morgan_model.n_features_in_ == MORGAN_NBITS,

    "MACCS expects 166 features":
        best_maccs_model.n_features_in_ == MACCS_NBITS,
}


for check_name, result in checks.items():

    symbol = "✓" if result else "✗"

    print(f"{symbol} {check_name}")


# ============================================================================
# FINAL DECISION
# ============================================================================

if all(checks.values()):

    print("\n" + "=" * 110)
    print("✓ ALL PRE-SCREENING CHECKS PASSED")
    print("=" * 110)

    print(
        "\nThe final Morgan and MACCS models are ready "
        "for COCONUT screening."
    )

else:

    print("\n" + "=" * 110)
    print("✗ PRE-SCREENING CHECK FAILED")
    print("=" * 110)

    raise RuntimeError(
        "One or more pre-screening checks failed. "
        "Do not proceed until corrected."
    )

FINAL PRE-SCREENING SUMMARY

Morgan:
  Model              : ExtraTreesClassifier
  Fingerprint        : Morgan
  Radius             : 3
  Number of bits     : 2048
  Classes            : [np.int64(0), np.int64(1)]
  Features expected  : 2048

MACCS:
  Model              : VotingClassifier
  Fingerprint        : MACCS
  Number of keys     : 166
  Classes            : [np.int64(0), np.int64(1)]
  Features expected  : 166

SCREENING READINESS
✓ Filtered COCONUT SDF exists
✓ Morgan model exists
✓ MACCS model exists
✓ Morgan model loaded
✓ MACCS model loaded
✓ Morgan has predict()
✓ Morgan has predict_proba()
✓ MACCS has predict()
✓ MACCS has predict_proba()
✓ Morgan expects 2048 features
✓ MACCS expects 166 features

✓ ALL PRE-SCREENING CHECKS PASSED

The final Morgan and MACCS models are ready for COCONUT screening.


In [10]:
# ============================================================================
# 12. CHECK FIRST 5 MOLECULES IN FILTERED COCONUT SDF
# ============================================================================

from rdkit import Chem
from rdkit.Chem import rdMolDescriptors


print("\n")
print("=" * 110)
print("FIRST 5 MOLECULES IN FILTERED COCONUT SDF")
print("=" * 110)

print(f"\nSDF file:")
print(SDF_FILE)


# ============================================================================
# LOAD FILTERED SDF
# ============================================================================

supplier = Chem.SDMolSupplier(
    SDF_FILE,
    removeHs=False,
    sanitize=True
)

count = 0

for mol in supplier:

    if mol is None:
        continue

    count += 1

    print("\n" + "-" * 110)
    print(f"Molecule {count}")
    print("-" * 110)

    # ------------------------------------------------------------------------
    # Molecule name / ID
    # ------------------------------------------------------------------------

    name = (
        mol.GetProp("_Name")
        if mol.HasProp("_Name")
        else "N/A"
    )

    print(f"Name/ID : {name}")

    # ------------------------------------------------------------------------
    # Number of atoms
    # ------------------------------------------------------------------------

    print(f"Atoms   : {mol.GetNumAtoms()}")

    # ------------------------------------------------------------------------
    # Number of bonds
    # ------------------------------------------------------------------------

    print(f"Bonds   : {mol.GetNumBonds()}")

    # ------------------------------------------------------------------------
    # Molecular formula
    # ------------------------------------------------------------------------

    formula = rdMolDescriptors.CalcMolFormula(mol)

    print(f"Formula : {formula}")

    # ------------------------------------------------------------------------
    # Canonical SMILES
    # ------------------------------------------------------------------------

    smiles = Chem.MolToSmiles(
        mol,
        isomericSmiles=True
    )

    print(f"SMILES  : {smiles}")

    # ------------------------------------------------------------------------
    # SDF properties
    # ------------------------------------------------------------------------

    print("\nProperties:")

    properties = mol.GetPropNames()

    if properties:

        for prop in properties:

            value = mol.GetProp(prop)

            print(f"  {prop}: {value}")

    else:

        print("  No additional SDF properties found.")

    # ------------------------------------------------------------------------
    # Stop after first 5 valid molecules
    # ------------------------------------------------------------------------

    if count == 5:
        break


# ============================================================================
# FINAL CHECK
# ============================================================================

print("\n" + "=" * 110)
print(f"✓ Displayed first {count} valid molecules")
print("=" * 110)



FIRST 5 MOLECULES IN FILTERED COCONUT SDF

SDF file:
coconut_analysis/3_filtering/coconut_filtered.sdf

--------------------------------------------------------------------------------------------------------------
Molecule 1
--------------------------------------------------------------------------------------------------------------
Name/ID : 
Atoms   : 32
Bonds   : 36
Formula : C18H26N6O8
SMILES  : NC1=NC(=O)N([C@H]2C[C@H](O)[C@@H](CO)O2)[C@@H]2[C@H]1[C@@H]1C(N)=NC(=O)N([C@H]3C[C@H](O)[C@@H](CO)O3)[C@@H]12

Properties:
  IDENTIFIER: CNP0082109.1

--------------------------------------------------------------------------------------------------------------
Molecule 2
--------------------------------------------------------------------------------------------------------------
Name/ID : 
Atoms   : 22
Bonds   : 25
Formula : C19H30O3
SMILES  : C[C@]12CC[C@H]3[C@@H](CC[C@H]4CC(=O)CC[C@@]43CO)[C@@H]1CC[C@@H]2O

Properties:
  IDENTIFIER: CNP0280604.1

------------------------------------

In [11]:
# ============================================================================
# COCONUT DATABASE SCREENING
# DIRECTORY CONFIGURATION
# ============================================================================

import os
import re
import numpy as np
import pandas as pd

from rdkit import Chem
from rdkit.Chem import AllChem, MACCSkeys
from rdkit.DataStructs import ConvertToNumpyArray


# ============================================================================
# 1. MAIN COCONUT ANALYSIS DIRECTORY
# ============================================================================

COCONUT_DIR = "coconut_analysis"


# ============================================================================
# 2. OUTPUT DIRECTORIES
# ============================================================================

INPUT_DIR = os.path.join(
    COCONUT_DIR,
    "1_input_data"
)

MODEL_MORGAN_DIR = os.path.join(
    COCONUT_DIR,
    "2_models",
    "Morgan"
)

MODEL_MACCS_DIR = os.path.join(
    COCONUT_DIR,
    "2_models",
    "MACCS"
)

FILTERING_DIR = os.path.join(
    COCONUT_DIR,
    "3_filtering"
)

MORGAN_SCREEN_DIR = os.path.join(
    COCONUT_DIR,
    "4_morgan_screening"
)

MACCS_SCREEN_DIR = os.path.join(
    COCONUT_DIR,
    "4_maccs_screening"
)

FINAL_CANDIDATES_DIR = os.path.join(
    COCONUT_DIR,
    "5_final_candidates"
)


# ============================================================================
# 3. CREATE DIRECTORIES
# ============================================================================

for folder in [
    INPUT_DIR,
    MODEL_MORGAN_DIR,
    MODEL_MACCS_DIR,
    FILTERING_DIR,
    MORGAN_SCREEN_DIR,
    MACCS_SCREEN_DIR,
    FINAL_CANDIDATES_DIR
]:

    os.makedirs(
        folder,
        exist_ok=True
    )


# ============================================================================
# 4. DISPLAY DIRECTORY STRUCTURE
# ============================================================================

print("=" * 100)
print("COCONUT ANALYSIS DIRECTORY STRUCTURE")
print("=" * 100)

print(f"\nMain directory:")
print(f"  {COCONUT_DIR}")

print(f"\nInput data:")
print(f"  {INPUT_DIR}")

print(f"\nMorgan models:")
print(f"  {MODEL_MORGAN_DIR}")

print(f"\nMACCS models:")
print(f"  {MODEL_MACCS_DIR}")

print(f"\nFiltering:")
print(f"  {FILTERING_DIR}")

print(f"\nMorgan screening:")
print(f"  {MORGAN_SCREEN_DIR}")

print(f"\nMACCS screening:")
print(f"  {MACCS_SCREEN_DIR}")

print(f"\nFinal candidates:")
print(f"  {FINAL_CANDIDATES_DIR}")

print("\n" + "=" * 100)
print("DIRECTORIES READY")
print("=" * 100)

COCONUT ANALYSIS DIRECTORY STRUCTURE

Main directory:
  coconut_analysis

Input data:
  coconut_analysis/1_input_data

Morgan models:
  coconut_analysis/2_models/Morgan

MACCS models:
  coconut_analysis/2_models/MACCS

Filtering:
  coconut_analysis/3_filtering

Morgan screening:
  coconut_analysis/4_morgan_screening

MACCS screening:
  coconut_analysis/4_maccs_screening

Final candidates:
  coconut_analysis/5_final_candidates

DIRECTORIES READY


In [12]:
# ============================================================================
# COCONUT DATABASE SCREENING
# FINAL STRATEGY:
#
#   TOP 500 FROM MORGAN
#          +
#   TOP 500 FROM MACCS
#          ↓
#       COMBINE
#          ↓
#   REMOVE DUPLICATE SMILES
#          ↓
#   FINAL UNIQUE CANDIDATES
#
# IMPORTANT:
#   The final number does NOT have to be 100.
#
#   Example:
#       Morgan Top 50 = 500
#       MACCS Top 50  = 500
#       Overlap       = 200
#       Final unique  = 800
#
#   Selection is based on model ranking, not an arbitrary probability
#   threshold.
#
# DIRECTORY STRUCTURE:
#
#   coconut_analysis/
#       ├── 1_input_data/
#       ├── 2_models/
#       │   ├── Morgan/
#       │   └── MACCS/
#       ├── 3_filtering/
#       ├── 4_morgan_screening/
#       ├── 4_maccs_screening/
#       └── 5_final_candidates/
#
# ============================================================================

import os
import re
import numpy as np
import pandas as pd

from rdkit import Chem
from rdkit.Chem import AllChem, MACCSkeys
from rdkit.DataStructs import ConvertToNumpyArray


# ============================================================================
# 1. DIRECTORY CONFIGURATION
# ============================================================================
#
# These directories were created in your previous setup cell.
# We define them here as well so this screening section is self-contained.
# ============================================================================

COCONUT_DIR = "coconut_analysis"

MORGAN_SCREEN_DIR = os.path.join(
    COCONUT_DIR,
    "4_morgan_screening"
)

MACCS_SCREEN_DIR = os.path.join(
    COCONUT_DIR,
    "4_maccs_screening"
)

FINAL_CANDIDATES_DIR = os.path.join(
    COCONUT_DIR,
    "5_final_candidates"
)


# Make sure the directories exist

os.makedirs(
    MORGAN_SCREEN_DIR,
    exist_ok=True
)

os.makedirs(
    MACCS_SCREEN_DIR,
    exist_ok=True
)

os.makedirs(
    FINAL_CANDIDATES_DIR,
    exist_ok=True
)


# ============================================================================
# 7. LOAD COCONUT SDF
# ============================================================================

print("\n")
print("=" * 110)
print("LOADING COCONUT SDF")
print("=" * 110)

supplier = Chem.SDMolSupplier(
    SDF_FILE,
    removeHs=False,
    sanitize=True
)

# Call len() to obtain total number of SDF records
total_sdf_records = len(supplier)

print(
    f"Total SDF records: "
    f"{total_sdf_records:,}"
)

# Re-instantiate supplier so iteration starts from the beginning
supplier = Chem.SDMolSupplier(
    SDF_FILE,
    removeHs=False,
    sanitize=True
)


# ============================================================================
# 8. PREPARE MOLECULES
# ============================================================================

valid_molecules = []
invalid_count = 0

print("\nProcessing molecules...")


# ============================================================================
# Possible COCONUT ID fields
# ============================================================================

possible_id_fields = [

    "IDENTIFIER",
    "identifier",
    "Identifier",

    "CNP_ID",
    "cnp_id",

    "COCONUT_ID",
    "coconut_id",

    "ID",
    "id"

]


# ============================================================================
# Regex pattern for COCONUT CNP ID
#
# Examples:
#
#   CNP0082109
#   CNP0082109.1
#
# Stored final ID:
#
#   CNP0082109
# ============================================================================

cnp_regex = re.compile(
    r"CNP\d{7}(?:\.\d+)?",
    re.IGNORECASE
)


# ============================================================================
# PROCESS EVERY SDF RECORD
# ============================================================================

for sdf_index, mol in enumerate(supplier):

    # ------------------------------------------------------------------------
    # Skip invalid SDF records
    # ------------------------------------------------------------------------

    if mol is None:

        invalid_count += 1
        continue


    try:

        # ====================================================================
        # Generate canonical SMILES
        # ====================================================================

        smiles = Chem.MolToSmiles(
            mol,
            canonical=True
        )

        if not smiles:

            invalid_count += 1
            continue


        # ====================================================================
        # Collect SDF properties
        # ====================================================================

        properties = {}

        for prop_name in mol.GetPropNames():

            try:

                properties[prop_name] = (
                    mol.GetProp(prop_name)
                )

            except Exception:

                properties[prop_name] = ""


        # ====================================================================
        # Identify COCONUT / CNP ID
        # ====================================================================

        cnp_id = ""


        # --------------------------------------------------------------------
        # Step 1:
        # Check preferred identifier fields
        # --------------------------------------------------------------------

        for field in possible_id_fields:

            if field in properties:

                val = str(
                    properties[field]
                ).strip()

                match = cnp_regex.search(val)

                if match:

                    # Example:
                    # CNP0082109.1 → CNP0082109

                    raw_cnp = (
                        match.group(0)
                        .upper()
                    )

                    cnp_id = (
                        raw_cnp
                        .split(".")[0]
                    )

                    break

                elif val and not cnp_id:

                    cnp_id = val


        # --------------------------------------------------------------------
        # Step 2:
        # Check RDKit molecule title (_Name)
        # --------------------------------------------------------------------

        if not cnp_id and mol.HasProp("_Name"):

            title = (
                mol.GetProp("_Name")
                .strip()
            )

            if title:

                match = cnp_regex.search(title)

                if match:

                    cnp_id = (
                        match.group(0)
                        .upper()
                        .split(".")[0]
                    )

                else:

                    cnp_id = title


        # --------------------------------------------------------------------
        # Step 3:
        # Scan all property values as fallback
        # --------------------------------------------------------------------

        if not cnp_id:

            for val in properties.values():

                match = cnp_regex.search(
                    str(val)
                )

                if match:

                    cnp_id = (
                        match.group(0)
                        .upper()
                        .split(".")[0]
                    )

                    break


        # --------------------------------------------------------------------
        # Step 4:
        # Final fallback ID
        # --------------------------------------------------------------------

        if not cnp_id:

            cnp_id = (
                f"COCONUT_SDF_{sdf_index + 1}"
            )


        # ====================================================================
        # Store molecule
        # ====================================================================

        valid_molecules.append({

            "SDF_Index":
                sdf_index + 1,

            "CNP_ID":
                cnp_id,

            "COCONUT_ID":
                cnp_id,

            "SMILES":
                smiles,

            "Molecule":
                mol,

            "SDF_Properties":
                properties

        })


    except Exception:

        invalid_count += 1


# ============================================================================
# PREPARATION SUMMARY
# ============================================================================

print(
    f"\nValid molecules   : "
    f"{len(valid_molecules):,}"
)

print(
    f"Invalid molecules : "
    f"{invalid_count:,}"
)


if len(valid_molecules) == 0:

    raise ValueError(
        "No valid molecules were found in the SDF file."
    )


# ============================================================================
# 9. GENERATE MORGAN FINGERPRINTS
# ============================================================================
#
# EXACT TRAINING SETTINGS:
#
#   Radius = 3
#   nBits  = 2048
#
# IMPORTANT:
#
#   morgan_valid_indices stores the position of each fingerprint
#   in valid_molecules.
#
# ============================================================================

print("\n")
print("=" * 110)
print("GENERATING MORGAN FINGERPRINTS")
print("=" * 110)


morgan_fingerprints = []

morgan_valid_indices = []

morgan_failed = 0


# ============================================================================
# Generate fingerprints
# ============================================================================

for i, item in enumerate(valid_molecules):

    mol = item["Molecule"]

    try:

        # --------------------------------------------------------------------
        # EXACT Morgan fingerprint settings used during model training
        # --------------------------------------------------------------------

        fp = AllChem.GetMorganFingerprintAsBitVect(

            mol,

            radius=3,

            nBits=2048

        )


        # --------------------------------------------------------------------
        # Convert RDKit fingerprint to NumPy array
        # --------------------------------------------------------------------

        arr = np.zeros(

            (2048,),

            dtype=np.int8

        )

        ConvertToNumpyArray(

            fp,

            arr

        )


        # --------------------------------------------------------------------
        # Store fingerprint
        # --------------------------------------------------------------------

        morgan_fingerprints.append(
            arr
        )

        # Store index linking fingerprint → valid_molecules
        morgan_valid_indices.append(
            i
        )


    except Exception:

        morgan_failed += 1


# ============================================================================
# Convert Morgan fingerprints to matrix
# ============================================================================

X_morgan_screen = np.asarray(

    morgan_fingerprints,

    dtype=np.int8

)


# ============================================================================
# Morgan summary
# ============================================================================

print(
    f"Morgan fingerprint matrix shape: "
    f"{X_morgan_screen.shape}"
)

print(
    f"Morgan fingerprint failures: "
    f"{morgan_failed:,}"
)


if len(X_morgan_screen) == 0:

    raise ValueError(
        "No valid Morgan fingerprints were generated."
    )


# ============================================================================
# Verify Morgan feature dimension
# ============================================================================

if X_morgan_screen.shape[1] != 2048:

    raise ValueError(

        f"Morgan fingerprint dimension mismatch. "
        f"Expected 2048, "
        f"got {X_morgan_screen.shape[1]}"

    )


# ============================================================================
# 10. GENERATE MACCS FINGERPRINTS
# ============================================================================
#
# RDKit produces 167 bits.
#
# Bit 0 is removed to reproduce the exact 166-feature representation
# used during MACCS model training.
#
# ============================================================================

print("\n")
print("=" * 110)
print("GENERATING MACCS FINGERPRINTS")
print("=" * 110)


maccs_fingerprints = []

maccs_valid_indices = []

maccs_failed = 0


# ============================================================================
# Generate MACCS fingerprints
# ============================================================================

for i, item in enumerate(valid_molecules):

    mol = item["Molecule"]

    try:

        # --------------------------------------------------------------------
        # Generate RDKit MACCS fingerprint
        # --------------------------------------------------------------------

        fp = MACCSkeys.GenMACCSKeys(
            mol
        )


        # --------------------------------------------------------------------
        # RDKit MACCS = 167 bits
        # --------------------------------------------------------------------

        arr = np.zeros(

            (167,),

            dtype=np.int8

        )

        ConvertToNumpyArray(

            fp,

            arr

        )


        # --------------------------------------------------------------------
        # Remove RDKit bit 0
        #
        # Result = 166 features
        # --------------------------------------------------------------------

        arr_166 = arr[1:]


        if len(arr_166) != 166:

            raise ValueError(

                f"Expected 166 MACCS features, "
                f"got {len(arr_166)}"

            )


        # --------------------------------------------------------------------
        # Store fingerprint
        # --------------------------------------------------------------------

        maccs_fingerprints.append(

            arr_166

        )

        # Store index linking fingerprint → valid_molecules
        maccs_valid_indices.append(

            i

        )


    except Exception:

        maccs_failed += 1


# ============================================================================
# Convert MACCS fingerprints to matrix
# ============================================================================

X_maccs_screen = np.asarray(

    maccs_fingerprints,

    dtype=np.int8

)


# ============================================================================
# MACCS summary
# ============================================================================

print(
    f"MACCS fingerprint matrix shape: "
    f"{X_maccs_screen.shape}"
)

print(
    f"MACCS fingerprint failures: "
    f"{maccs_failed:,}"
)


if len(X_maccs_screen) == 0:

    raise ValueError(
        "No valid MACCS fingerprints were generated."
    )


# ============================================================================
# Verify MACCS feature dimension
# ============================================================================

if X_maccs_screen.shape[1] != 166:

    raise ValueError(

        f"MACCS fingerprint dimension mismatch. "
        f"Expected 166, "
        f"got {X_maccs_screen.shape[1]}"

    )


# ============================================================================
# 11. FINAL PREPARATION SUMMARY
# ============================================================================

print("\n")
print("=" * 110)
print("COCONUT SCREENING PREPARATION COMPLETE")
print("=" * 110)

print(
    f"Total SDF records       : "
    f"{total_sdf_records:,}"
)

print(
    f"Valid molecules         : "
    f"{len(valid_molecules):,}"
)

print(
    f"Morgan fingerprints     : "
    f"{len(morgan_valid_indices):,}"
)

print(
    f"MACCS fingerprints      : "
    f"{len(maccs_valid_indices):,}"
)

print(
    f"Morgan features         : "
    f"{X_morgan_screen.shape[1]}"
)

print(
    f"MACCS features          : "
    f"{X_maccs_screen.shape[1]}"
)

print("\nOutput directories:")

print(
    f"Morgan screening : "
    f"{MORGAN_SCREEN_DIR}"
)

print(
    f"MACCS screening  : "
    f"{MACCS_SCREEN_DIR}"
)

print(
    f"Final candidates : "
    f"{FINAL_CANDIDATES_DIR}"
)

print("\n")
print("=" * 110)
print("READY FOR MODEL PREDICTION AND TOP-500 RANKING")
print("=" * 110)



LOADING COCONUT SDF
Total SDF records: 182,740

Processing molecules...

Valid molecules   : 182,740
Invalid molecules : 0


GENERATING MORGAN FINGERPRINTS


[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerator
[20:33:19] DEPRECATION WARNING: please use MorganGenerat

Morgan fingerprint matrix shape: (182740, 2048)
Morgan fingerprint failures: 0


GENERATING MACCS FINGERPRINTS
MACCS fingerprint matrix shape: (182740, 166)
MACCS fingerprint failures: 0


COCONUT SCREENING PREPARATION COMPLETE
Total SDF records       : 182,740
Valid molecules         : 182,740
Morgan fingerprints     : 182,740
MACCS fingerprints      : 182,740
Morgan features         : 2048
MACCS features          : 166

Output directories:
Morgan screening : coconut_analysis/4_morgan_screening
MACCS screening  : coconut_analysis/4_maccs_screening
Final candidates : coconut_analysis/5_final_candidates


READY FOR MODEL PREDICTION AND TOP-500 RANKING


In [13]:
# ============================================================================
# 11. CHECK FINGERPRINT DIMENSIONS
# ============================================================================

print("\n")
print("=" * 110)
print("CHECKING FINGERPRINT DIMENSIONS")
print("=" * 110)

print(
    f"Morgan screening features : "
    f"{X_morgan_screen.shape[1]}"
)

print(
    f"Expected Morgan features  : "
    f"2048"
)

print(
    f"MACCS screening features  : "
    f"{X_maccs_screen.shape[1]}"
)

print(
    f"Expected MACCS features   : "
    f"166"
)


# ----------------------------------------------------------------------------
# Verify Morgan dimensions
# ----------------------------------------------------------------------------

if X_morgan_screen.shape[1] != 2048:

    raise ValueError(
        "Morgan fingerprint dimension is incorrect."
    )


# ----------------------------------------------------------------------------
# Verify MACCS dimensions
# ----------------------------------------------------------------------------

if X_maccs_screen.shape[1] != 166:

    raise ValueError(
        "MACCS fingerprint dimension is incorrect."
    )


print("\n✓ Fingerprint dimensions are correct.")


# ============================================================================
# 11A. IDENTIFY ACTIVE CLASS INDEX
# ============================================================================

print("\n")
print("=" * 110)
print("IDENTIFYING ACTIVE CLASS INDEX")
print("=" * 110)


# ----------------------------------------------------------------------------
# Morgan
# ----------------------------------------------------------------------------

if not hasattr(
    best_morgan_model,
    "classes_"
):

    raise ValueError(
        "Morgan model does not have classes_."
    )


print(
    f"Morgan model classes: "
    f"{best_morgan_model.classes_}"
)


if 1 not in best_morgan_model.classes_:

    raise ValueError(
        "Active class (1) was not found in Morgan model classes."
    )


morgan_active_index = list(
    best_morgan_model.classes_
).index(1)


print(
    f"Morgan Active class index: "
    f"{morgan_active_index}"
)


# ----------------------------------------------------------------------------
# MACCS
# ----------------------------------------------------------------------------

if not hasattr(
    best_maccs_model,
    "classes_"
):

    raise ValueError(
        "MACCS model does not have classes_."
    )


print(
    f"MACCS model classes: "
    f"{best_maccs_model.classes_}"
)


if 1 not in best_maccs_model.classes_:

    raise ValueError(
        "Active class (1) was not found in MACCS model classes."
    )


maccs_active_index = list(
    best_maccs_model.classes_
).index(1)


print(
    f"MACCS Active class index: "
    f"{maccs_active_index}"
)


# ============================================================================
# 12. MORGAN PREDICTION
# ============================================================================

print("\n")
print("=" * 110)
print("PREDICTING COCONUT MOLECULES — MORGAN")
print("=" * 110)


# ----------------------------------------------------------------------------
# Check probability support
# ----------------------------------------------------------------------------

if not hasattr(
    best_morgan_model,
    "predict_proba"
):

    raise ValueError(
        "Morgan model does not provide predict_proba()."
    )


# ----------------------------------------------------------------------------
# Predict classes
# ----------------------------------------------------------------------------

morgan_predictions = (
    best_morgan_model.predict(
        X_morgan_screen
    )
)


# ----------------------------------------------------------------------------
# Predict Active probabilities
# ----------------------------------------------------------------------------

morgan_probabilities = (
    best_morgan_model
    .predict_proba(
        X_morgan_screen
    )[
        :,
        morgan_active_index
    ]
)


print(
    f"Morgan predictions completed: "
    f"{len(morgan_predictions):,}"
)

print(
    f"Morgan Active probability range: "
    f"{morgan_probabilities.min():.6f} "
    f"to "
    f"{morgan_probabilities.max():.6f}"
)


# ============================================================================
# 13. MACCS PREDICTION
# ============================================================================

print("\n")
print("=" * 110)
print("PREDICTING COCONUT MOLECULES — MACCS")
print("=" * 110)


# ----------------------------------------------------------------------------
# Check probability support
# ----------------------------------------------------------------------------

if not hasattr(
    best_maccs_model,
    "predict_proba"
):

    raise ValueError(
        "MACCS model does not provide predict_proba()."
    )


# ----------------------------------------------------------------------------
# Predict classes
# ----------------------------------------------------------------------------

maccs_predictions = (
    best_maccs_model.predict(
        X_maccs_screen
    )
)


# ----------------------------------------------------------------------------
# Predict Active probabilities
# ----------------------------------------------------------------------------

maccs_probabilities = (
    best_maccs_model
    .predict_proba(
        X_maccs_screen
    )[
        :,
        maccs_active_index
    ]
)


print(
    f"MACCS predictions completed: "
    f"{len(maccs_predictions):,}"
)

print(
    f"MACCS Active probability range: "
    f"{maccs_probabilities.min():.6f} "
    f"to "
    f"{maccs_probabilities.max():.6f}"
)


# ============================================================================
# FINAL PREDICTION CHECK
# ============================================================================

print("\n")
print("=" * 110)
print("PREDICTION CHECK")
print("=" * 110)

print(
    f"Number of COCONUT molecules : "
    f"{len(valid_molecules):,}"
)

print(
    f"Morgan predictions          : "
    f"{len(morgan_predictions):,}"
)

print(
    f"Morgan probabilities        : "
    f"{len(morgan_probabilities):,}"
)

print(
    f"MACCS predictions           : "
    f"{len(maccs_predictions):,}"
)

print(
    f"MACCS probabilities         : "
    f"{len(maccs_probabilities):,}"
)


# ----------------------------------------------------------------------------
# Verify that every molecule received a prediction
# ----------------------------------------------------------------------------

if len(morgan_predictions) != len(valid_molecules):

    raise ValueError(
        "Morgan prediction count does not match the number "
        "of valid COCONUT molecules."
    )


if len(maccs_predictions) != len(valid_molecules):

    raise ValueError(
        "MACCS prediction count does not match the number "
        "of valid COCONUT molecules."
    )


if len(morgan_probabilities) != len(valid_molecules):

    raise ValueError(
        "Morgan probability count does not match the number "
        "of valid COCONUT molecules."
    )


if len(maccs_probabilities) != len(valid_molecules):

    raise ValueError(
        "MACCS probability count does not match the number "
        "of valid COCONUT molecules."
    )


print("\n✓ All prediction counts are correct.")
print("✓ Morgan and MACCS predictions are ready for ranking.")



CHECKING FINGERPRINT DIMENSIONS
Morgan screening features : 2048
Expected Morgan features  : 2048
MACCS screening features  : 166
Expected MACCS features   : 166

✓ Fingerprint dimensions are correct.


IDENTIFYING ACTIVE CLASS INDEX
Morgan model classes: [0 1]
Morgan Active class index: 1
MACCS model classes: [0 1]
MACCS Active class index: 1


PREDICTING COCONUT MOLECULES — MORGAN
Morgan predictions completed: 182,740
Morgan Active probability range: 0.009571 to 0.998317


PREDICTING COCONUT MOLECULES — MACCS
MACCS predictions completed: 182,740
MACCS Active probability range: 0.001555 to 0.993722


PREDICTION CHECK
Number of COCONUT molecules : 182,740
Morgan predictions          : 182,740
Morgan probabilities        : 182,740
MACCS predictions           : 182,740
MACCS probabilities         : 182,740

✓ All prediction counts are correct.
✓ Morgan and MACCS predictions are ready for ranking.


In [14]:
# ============================================================================
# 14. CREATE MORGAN RESULTS TABLE
# ============================================================================

print("\n")
print("=" * 110)
print("CREATING MORGAN RESULTS TABLE")
print("=" * 110)

morgan_results = []

for position, original_index in enumerate(
    morgan_valid_indices
):

    item = valid_molecules[
        original_index
    ]

    prediction = morgan_predictions[
        position
    ]

    probability = morgan_probabilities[
        position
    ]

    morgan_results.append({

        "SDF_Index":
            item["SDF_Index"],

        "CNP_ID":
            item["CNP_ID"],

        "COCONUT_ID":
            item["COCONUT_ID"],

        "SMILES":
            item["SMILES"],

        "Morgan_Prediction":
            str(prediction),

        "Morgan_Active_Probability":
            float(probability)

    })


morgan_results_df = pd.DataFrame(
    morgan_results
)


print(
    f"Morgan results created: "
    f"{len(morgan_results_df):,}"
)


# ============================================================================
# 15. RANK ALL MOLECULES BY MORGAN
# ============================================================================

morgan_results_df = (
    morgan_results_df
    .sort_values(
        by="Morgan_Active_Probability",
        ascending=False
    )
    .reset_index(drop=True)
)


morgan_results_df[
    "Morgan_Rank"
] = np.arange(
    1,
    len(morgan_results_df) + 1
)


print(
    f"Morgan molecules ranked: "
    f"{len(morgan_results_df):,}"
)


# ----------------------------------------------------------------------------
# SAVE COMPLETE MORGAN SCREENING RESULTS
# ----------------------------------------------------------------------------

morgan_ranked_file = os.path.join(
    MORGAN_SCREEN_DIR,
    "coconut_morgan_ranked.csv"
)

morgan_results_df.to_csv(
    morgan_ranked_file,
    index=False
)

print(
    f"Morgan ranked results saved to:\n"
    f"{morgan_ranked_file}"
)


# ============================================================================
# 16. CREATE MACCS RESULTS TABLE
# ============================================================================

print("\n")
print("=" * 110)
print("CREATING MACCS RESULTS TABLE")
print("=" * 110)

maccs_results = []

for position, original_index in enumerate(
    maccs_valid_indices
):

    item = valid_molecules[
        original_index
    ]

    prediction = maccs_predictions[
        position
    ]

    probability = maccs_probabilities[
        position
    ]

    maccs_results.append({

        "SDF_Index":
            item["SDF_Index"],

        "CNP_ID":
            item["CNP_ID"],

        "COCONUT_ID":
            item["COCONUT_ID"],

        "SMILES":
            item["SMILES"],

        "MACCS_Prediction":
            str(prediction),

        "MACCS_Active_Probability":
            float(probability)

    })


maccs_results_df = pd.DataFrame(
    maccs_results
)


print(
    f"MACCS results created: "
    f"{len(maccs_results_df):,}"
)


# ============================================================================
# 17. RANK ALL MOLECULES BY MACCS
# ============================================================================

maccs_results_df = (
    maccs_results_df
    .sort_values(
        by="MACCS_Active_Probability",
        ascending=False
    )
    .reset_index(drop=True)
)


maccs_results_df[
    "MACCS_Rank"
] = np.arange(
    1,
    len(maccs_results_df) + 1
)


print(
    f"MACCS molecules ranked: "
    f"{len(maccs_results_df):,}"
)


# ----------------------------------------------------------------------------
# SAVE COMPLETE MACCS SCREENING RESULTS
# ----------------------------------------------------------------------------

maccs_ranked_file = os.path.join(
    MACCS_SCREEN_DIR,
    "coconut_maccs_ranked.csv"
)

maccs_results_df.to_csv(
    maccs_ranked_file,
    index=False
)

print(
    f"MACCS ranked results saved to:\n"
    f"{maccs_ranked_file}"
)


# ============================================================================
# 18. SELECT TOP 50 MORGAN
# ============================================================================

TOP_N = 500


top50_morgan_df = (
    morgan_results_df
    .head(TOP_N)
    .copy()
)


print("\n")
print("=" * 110)
print("TOP 50 MORGAN CANDIDATES")
print("=" * 110)

print(
    top50_morgan_df[
        [
            "Morgan_Rank",
            "CNP_ID",
            "COCONUT_ID",
            "Morgan_Prediction",
            "Morgan_Active_Probability",
            "SMILES"
        ]
    ]
    .to_string(
        index=False,
        float_format=lambda x: f"{x:.4f}"
    )
)


# ----------------------------------------------------------------------------
# SAVE TOP 50 MORGAN
# ----------------------------------------------------------------------------

top50_morgan_file = os.path.join(
    MORGAN_SCREEN_DIR,
    "coconut_morgan_top50.csv"
)

top50_morgan_df.to_csv(
    top50_morgan_file,
    index=False
)

print(
    f"\nMorgan Top 50 saved to:\n"
    f"{top50_morgan_file}"
)


# ============================================================================
# 19. SELECT TOP 50 MACCS
# ============================================================================

top50_maccs_df = (
    maccs_results_df
    .head(TOP_N)
    .copy()
)


print("\n")
print("=" * 110)
print("TOP 50 MACCS CANDIDATES")
print("=" * 110)

print(
    top50_maccs_df[
        [
            "MACCS_Rank",
            "CNP_ID",
            "COCONUT_ID",
            "MACCS_Prediction",
            "MACCS_Active_Probability",
            "SMILES"
        ]
    ]
    .to_string(
        index=False,
        float_format=lambda x: f"{x:.4f}"
    )
)


# ----------------------------------------------------------------------------
# SAVE TOP 50 MACCS
# ----------------------------------------------------------------------------

top50_maccs_file = os.path.join(
    MACCS_SCREEN_DIR,
    "coconut_maccs_top50.csv"
)

top50_maccs_df.to_csv(
    top50_maccs_file,
    index=False
)

print(
    f"\nMACCS Top 50 saved to:\n"
    f"{top50_maccs_file}"
)


# ============================================================================
# 20. PREPARE TOP-50 LISTS FOR UNION
# ============================================================================

print("\n")
print("=" * 110)
print("PREPARING MORGAN + MACCS TOP-50 UNION")
print("=" * 110)


morgan_selection = top50_morgan_df[
    [
        "SDF_Index",
        "CNP_ID",
        "COCONUT_ID",
        "SMILES",
        "Morgan_Rank",
        "Morgan_Prediction",
        "Morgan_Active_Probability"
    ]
].copy()


maccs_selection = top50_maccs_df[
    [
        "SDF_Index",
        "CNP_ID",
        "COCONUT_ID",
        "SMILES",
        "MACCS_Rank",
        "MACCS_Prediction",
        "MACCS_Active_Probability"
    ]
].copy()


print(
    f"Morgan Top 50 : "
    f"{len(morgan_selection)}"
)

print(
    f"MACCS Top 50  : "
    f"{len(maccs_selection)}"
)


# ============================================================================
# 21. UNION OF MORGAN TOP 50 + MACCS TOP 50
# ============================================================================

print("\n")
print("=" * 110)
print("CREATING FINAL UNION")
print("=" * 110)


# ----------------------------------------------------------------------------
# Outer merge = UNION
#
# A molecule appearing in:
#   Morgan only       → retained
#   MACCS only        → retained
#   Morgan + MACCS   → retained once
#
# SMILES is used as the molecular identity.
# ----------------------------------------------------------------------------

combined_top50_df = pd.merge(

    morgan_selection,

    maccs_selection,

    on="SMILES",

    how="outer",

    suffixes=(
        "_Morgan",
        "_MACCS"
    )
)


# ============================================================================
# 21A. COMBINE MOLECULE IDENTIFICATION INFORMATION
# ============================================================================

combined_top50_df[
    "SDF_Index"
] = (
    combined_top50_df[
        "SDF_Index_Morgan"
    ]
    .combine_first(
        combined_top50_df[
            "SDF_Index_MACCS"
        ]
    )
)


combined_top50_df[
    "CNP_ID"
] = (
    combined_top50_df[
        "CNP_ID_Morgan"
    ]
    .combine_first(
        combined_top50_df[
            "CNP_ID_MACCS"
        ]
    )
)


combined_top50_df[
    "COCONUT_ID"
] = (
    combined_top50_df[
        "COCONUT_ID_Morgan"
    ]
    .combine_first(
        combined_top50_df[
            "COCONUT_ID_MACCS"
        ]
    )
)


# ============================================================================
# 21B. IDENTIFY HOW EACH MOLECULE WAS SELECTED
# ============================================================================

combined_top50_df[
    "Selected_By"
] = np.select(

    [
        combined_top50_df[
            "Morgan_Rank"
        ].notna()
        &
        combined_top50_df[
            "MACCS_Rank"
        ].notna(),

        combined_top50_df[
            "Morgan_Rank"
        ].notna(),

        combined_top50_df[
            "MACCS_Rank"
        ].notna()
    ],

    [
        "Morgan + MACCS",
        "Morgan",
        "MACCS"
    ],

    default="Unknown"
)


# ============================================================================
# 21C. COMBINED PROBABILITY INFORMATION
# ============================================================================

combined_top50_df[
    "Mean_Active_Probability"
] = combined_top50_df[
    [
        "Morgan_Active_Probability",
        "MACCS_Active_Probability"
    ]
].mean(
    axis=1,
    skipna=True
)


combined_top50_df[
    "Min_Active_Probability"
] = combined_top50_df[
    [
        "Morgan_Active_Probability",
        "MACCS_Active_Probability"
    ]
].min(
    axis=1,
    skipna=True
)


# ============================================================================
# 21D. REMOVE DUPLICATE MOLECULES
# ============================================================================

combined_top50_df = (
    combined_top50_df
    .drop_duplicates(
        subset="SMILES",
        keep="first"
    )
    .reset_index(drop=True)
)


# ============================================================================
# 21E. RESTORE ORIGINAL COCONUT SDF INFORMATION
# ============================================================================

print("\n")
print("=" * 110)
print("ADDING ORIGINAL COCONUT MOLECULE INFORMATION")
print("=" * 110)


# Create lookup from SDF index to original molecule information

molecule_lookup = {
    item["SDF_Index"]: item
    for item in valid_molecules
}


# ----------------------------------------------------------------------------
# Collect original SDF properties for final candidates
# ----------------------------------------------------------------------------

original_properties = []

for sdf_index in combined_top50_df[
    "SDF_Index"
]:

    item = molecule_lookup.get(
        sdf_index
    )

    if item is None:

        original_properties.append({})

    else:

        original_properties.append(
            item.get(
                "SDF_Properties",
                {}
            )
        )


properties_df = pd.DataFrame(
    original_properties
)


# ----------------------------------------------------------------------------
# Prefix original SDF property columns
# ----------------------------------------------------------------------------

if not properties_df.empty:

    properties_df = properties_df.add_prefix(
        "COCONUT_"
    )


# ============================================================================
# 21F. COMBINE MODEL RESULTS + ORIGINAL MOLECULE INFORMATION
# ============================================================================

final_candidates_df = pd.concat(
    [
        combined_top50_df.reset_index(drop=True),
        properties_df.reset_index(drop=True)
    ],
    axis=1
)


# ============================================================================
# 21G. FINAL COLUMN ORDER
# ============================================================================

priority_columns = [

    "SDF_Index",
    "CNP_ID",
    "COCONUT_ID",
    "SMILES",

    "Selected_By",

    "Morgan_Rank",
    "Morgan_Prediction",
    "Morgan_Active_Probability",

    "MACCS_Rank",
    "MACCS_Prediction",
    "MACCS_Active_Probability",

    "Mean_Active_Probability",
    "Min_Active_Probability"
]


# Keep only priority columns that actually exist

priority_columns = [
    col
    for col in priority_columns
    if col in final_candidates_df.columns
]


remaining_columns = [
    col
    for col in final_candidates_df.columns
    if col not in priority_columns
]


final_candidates_df = final_candidates_df[
    priority_columns + remaining_columns
]


# ============================================================================
# 21H. FINAL QUALITY CONTROL
# ============================================================================

print("\n")
print("=" * 110)
print("FINAL CANDIDATE QUALITY CONTROL")
print("=" * 110)


total_morgan = len(
    top50_morgan_df
)

total_maccs = len(
    top50_maccs_df
)

total_union = len(
    final_candidates_df
)

duplicate_count = (
    final_candidates_df[
        "SMILES"
    ]
    .duplicated()
    .sum()
)

overlap_count = (
    (
        final_candidates_df[
            "Selected_By"
        ]
        == "Morgan + MACCS"
    )
    .sum()
)


print(
    f"Morgan Top 50              : "
    f"{total_morgan}"
)

print(
    f"MACCS Top 50               : "
    f"{total_maccs}"
)

print(
    f"Maximum possible union     : "
    f"{total_morgan + total_maccs}"
)

print(
    f"Morgan + MACCS overlap     : "
    f"{overlap_count}"
)

print(
    f"Final unique candidates    : "
    f"{total_union}"
)

print(
    f"Duplicate SMILES remaining : "
    f"{duplicate_count}"
)


# ----------------------------------------------------------------------------
# Verify no duplicates remain
# ----------------------------------------------------------------------------

if duplicate_count != 0:

    raise ValueError(
        "Duplicate SMILES remain in final candidate list."
    )


# ============================================================================
# 21I. SAVE FINAL CANDIDATES
# ============================================================================

final_candidates_file = os.path.join(
    FINAL_CANDIDATES_DIR,
    "coconut_final_unique_candidates.csv"
)


final_candidates_df.to_csv(
    final_candidates_file,
    index=False
)


print("\n")
print("=" * 110)
print("FINAL CANDIDATE FILE SAVED")
print("=" * 110)

print(
    f"File:\n"
    f"{final_candidates_file}"
)

print(
    f"\nFinal unique candidates: "
    f"{len(final_candidates_df)}"
)

print("\n✓ Morgan Top 50 saved separately.")
print("✓ MACCS Top 50 saved separately.")
print("✓ Final candidates are the UNION of both Top 50 lists.")
print("✓ Duplicate molecules removed using SMILES.")
print("✓ Original COCONUT SDF properties retained.")
print("✓ No probability cutoff was applied.")



CREATING MORGAN RESULTS TABLE
Morgan results created: 182,740
Morgan molecules ranked: 182,740
Morgan ranked results saved to:
coconut_analysis/4_morgan_screening/coconut_morgan_ranked.csv


CREATING MACCS RESULTS TABLE
MACCS results created: 182,740
MACCS molecules ranked: 182,740
MACCS ranked results saved to:
coconut_analysis/4_maccs_screening/coconut_maccs_ranked.csv


TOP 50 MORGAN CANDIDATES
 Morgan_Rank     CNP_ID COCONUT_ID Morgan_Prediction  Morgan_Active_Probability                                                                                                SMILES
           1 CNP0587381 CNP0587381                 1                     0.9983                                         Cc1cc(N2CCN([C@@H]3CN[C@H](C(=O)N4CCSC4)C3)CC2)n(-c2ccccc2)n1
           2 CNP0517376 CNP0517376                 1                     0.9646                                    CS(=O)(=O)c1cccc(C(=O)NC[C@@H]2CCCN2C(=O)C[C@H](N)Cc2cccc(Cl)c2)c1
           3 CNP0578278 CNP0578278                 

In [15]:
# ============================================================================
# FINAL SCREENING SUMMARY
# ============================================================================

summary_file = os.path.join(
    FINAL_CANDIDATES_DIR,
    "screening_summary.txt"
)

# Calculate Morgan/MACCS overlap directly
morgan_smiles = set(
    top50_morgan_df["SMILES"].dropna()
)

maccs_smiles = set(
    top50_maccs_df["SMILES"].dropna()
)

overlap_count = len(
    morgan_smiles.intersection(maccs_smiles)
)

with open(summary_file, "w") as f:

    f.write("COCONUT DATABASE SCREENING SUMMARY\n")
    f.write("=" * 80 + "\n\n")

    # ------------------------------------------------------------------------
    # INPUT DATA
    # ------------------------------------------------------------------------

    f.write("1. INPUT DATABASE\n")
    f.write("-" * 80 + "\n")
    f.write(f"Input SDF file           : {SDF_FILE}\n")
    f.write(
        f"Total SDF records        : "
        f"{total_sdf_records:,}\n"
    )
    f.write(
        f"Valid molecules screened : "
        f"{len(valid_molecules):,}\n"
    )
    f.write(
        f"Invalid molecules        : "
        f"{invalid_count:,}\n\n"
    )

    # ------------------------------------------------------------------------
    # FINGERPRINTS
    # ------------------------------------------------------------------------

    f.write("2. MOLECULAR FINGERPRINTS\n")
    f.write("-" * 80 + "\n")
    f.write(
        "Morgan fingerprint        : Radius = 3, nBits = 2048\n"
    )
    f.write(
        "MACCS fingerprint         : 166 features\n\n"
    )

    # ------------------------------------------------------------------------
    # MORGAN
    # ------------------------------------------------------------------------

    f.write("3. MORGAN SCREENING\n")
    f.write("-" * 80 + "\n")
    f.write(
        f"Molecules ranked         : "
        f"{len(morgan_results_df):,}\n"
    )
    f.write(
        f"Top candidates selected  : "
        f"{len(top50_morgan_df):,}\n"
    )
    f.write(
        f"Ranked results file      : "
        f"{morgan_ranked_file}\n"
    )
    f.write(
        f"Top 50 file              : "
        f"{top50_morgan_file}\n\n"
    )

    # ------------------------------------------------------------------------
    # MACCS
    # ------------------------------------------------------------------------

    f.write("4. MACCS SCREENING\n")
    f.write("-" * 80 + "\n")
    f.write(
        f"Molecules ranked         : "
        f"{len(maccs_results_df):,}\n"
    )
    f.write(
        f"Top candidates selected  : "
        f"{len(top50_maccs_df):,}\n"
    )
    f.write(
        f"Ranked results file      : "
        f"{maccs_ranked_file}\n"
    )
    f.write(
        f"Top 50 file              : "
        f"{top50_maccs_file}\n\n"
    )

    # ------------------------------------------------------------------------
    # FINAL UNION
    # ------------------------------------------------------------------------

    f.write("5. FINAL CANDIDATE SELECTION\n")
    f.write("-" * 80 + "\n")

    f.write(
        "Morgan selection         : Top 50\n"
    )

    f.write(
        "MACCS selection          : Top 50\n"
    )

    f.write(
        "Combination method       : UNION\n"
    )

    f.write(
        "Duplicate removal        : Canonical SMILES\n"
    )

    f.write(
        f"Morgan/MACCS overlap     : "
        f"{overlap_count:,}\n"
    )

    f.write(
        f"Final unique candidates  : "
        f"{len(final_candidates_df):,}\n"
    )

    f.write(
        f"Final candidate file     : "
        f"{final_candidates_file}\n\n"
    )

    # ------------------------------------------------------------------------
    # METHODOLOGICAL NOTES
    # ------------------------------------------------------------------------

    f.write("6. METHODOLOGICAL NOTES\n")
    f.write("-" * 80 + "\n")

    f.write(
        "• Morgan Top 50 selected by Morgan Active probability.\n"
    )

    f.write(
        "• MACCS Top 50 selected by MACCS Active probability.\n"
    )

    f.write(
        "• Both Top-50 lists were combined using UNION.\n"
    )

    f.write(
        "• Duplicate molecules were removed using canonical SMILES.\n"
    )

    f.write(
        "• Original COCONUT SDF information was retained.\n"
    )

    f.write(
        "• No artificial combined ranking was applied.\n"
    )

    f.write(
        "• No probability cutoff was applied.\n"
    )

    f.write(
        "• Mean and minimum probabilities are descriptive only.\n"
    )


# ============================================================================
# DISPLAY SUMMARY
# ============================================================================

print("\n")
print("=" * 110)
print("FINAL SCREENING SUMMARY")
print("=" * 110)

print(
    f"\nTotal valid molecules screened : "
    f"{len(valid_molecules):,}"
)

print(
    f"Morgan Top 50                  : "
    f"{len(top50_morgan_df):,}"
)

print(
    f"MACCS Top 50                   : "
    f"{len(top50_maccs_df):,}"
)

print(
    f"Morgan/MACCS overlap           : "
    f"{overlap_count:,}"
)

print(
    f"Final unique candidates        : "
    f"{len(final_candidates_df):,}"
)

print(
    f"\nFinal candidate file:\n"
    f"{final_candidates_file}"
)

print(
    f"\nSummary saved to:\n"
    f"{summary_file}"
)

print("\n✓ Screening summary completed successfully.")



FINAL SCREENING SUMMARY

Total valid molecules screened : 182,740
Morgan Top 50                  : 500
MACCS Top 50                   : 500
Morgan/MACCS overlap           : 97
Final unique candidates        : 903

Final candidate file:
coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv

Summary saved to:
coconut_analysis/5_final_candidates/screening_summary.txt

✓ Screening summary completed successfully.


# *Coconut analysis Completed*

Now post screening not compusary

In [16]:
# ============================================================================
# CREATE POST-SCREENING ANALYSIS DIRECTORY
# ============================================================================

POST_SCREENING_DIR = os.path.join(
    COCONUT_DIR,
    "6_post_screening_analysis"
)

os.makedirs(
    POST_SCREENING_DIR,
    exist_ok=True
)

print("=" * 100)
print("POST-SCREENING ANALYSIS DIRECTORY")
print("=" * 100)

print(f"\nDirectory created/verified:")
print(POST_SCREENING_DIR)

print("\n✓ Ready for post-screening analyses.")

POST-SCREENING ANALYSIS DIRECTORY

Directory created/verified:
coconut_analysis/6_post_screening_analysis

✓ Ready for post-screening analyses.


In [17]:
# ============================================================================
# POST-SCREENING ANALYSIS
# COCONUT DPP4 SCREENING
#
# Input:
#   5_final_candidates/coconut_final_unique_candidates.csv
#
# Output:
#   6_post_screening_analysis/
#
# IMPORTANT:
#   These analyses DO NOT modify the final candidate selection.
# ============================================================================

import os
import re
import warnings
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt

from rdkit import Chem
from rdkit.Chem import (
    Descriptors,
    Crippen,
    Lipinski,
    rdMolDescriptors,
    QED,
    rdFingerprintGenerator
)
from rdkit.Chem.Scaffolds import MurckoScaffold
from rdkit.Chem.FilterCatalog import (
    FilterCatalog,
    FilterCatalogParams
)
from rdkit.DataStructs import (
    TanimotoSimilarity,
    BulkTanimotoSimilarity,
    ConvertToNumpyArray
)

from sklearn.decomposition import PCA

warnings.filterwarnings("ignore")


# ============================================================================
# 1. CREATE POST-SCREENING ANALYSIS DIRECTORIES
# ============================================================================

POST_SCREENING_DIR = os.path.join(
    COCONUT_DIR,
    "6_post_screening_analysis"
)

QC_DIR = os.path.join(
    POST_SCREENING_DIR,
    "01_quality_control"
)

DESCRIPTOR_DIR = os.path.join(
    POST_SCREENING_DIR,
    "02_molecular_descriptors"
)

LIPINSKI_DIR = os.path.join(
    POST_SCREENING_DIR,
    "03_lipinski_analysis"
)

PAINS_DIR = os.path.join(
    POST_SCREENING_DIR,
    "04_pains_analysis"
)

MODEL_COMPARISON_DIR = os.path.join(
    POST_SCREENING_DIR,
    "05_morgan_maccs_comparison"
)

DIVERSITY_DIR = os.path.join(
    POST_SCREENING_DIR,
    "06_chemical_diversity"
)

SCAFFOLD_DIR = os.path.join(
    POST_SCREENING_DIR,
    "07_scaffold_analysis"
)

SIMILARITY_DIR = os.path.join(
    POST_SCREENING_DIR,
    "08_similarity_to_dpp4_actives"
)

CHEMICAL_SPACE_DIR = os.path.join(
    POST_SCREENING_DIR,
    "09_chemical_space_analysis"
)


for directory in [
    POST_SCREENING_DIR,
    QC_DIR,
    DESCRIPTOR_DIR,
    LIPINSKI_DIR,
    PAINS_DIR,
    MODEL_COMPARISON_DIR,
    DIVERSITY_DIR,
    SCAFFOLD_DIR,
    SIMILARITY_DIR,
    CHEMICAL_SPACE_DIR
]:
    os.makedirs(
        directory,
        exist_ok=True
    )


print("=" * 110)
print("POST-SCREENING ANALYSIS DIRECTORIES READY")
print("=" * 110)

print(
    f"\nMain directory:\n"
    f"{POST_SCREENING_DIR}"
)


# ============================================================================
# 2. LOAD FINAL CANDIDATES
# ============================================================================

FINAL_CANDIDATE_FILE = os.path.join(
    FINAL_CANDIDATES_DIR,
    "coconut_final_unique_candidates.csv"
)

final_df = pd.read_csv(
    FINAL_CANDIDATE_FILE
)

print("\n")
print("=" * 110)
print("FINAL CANDIDATES LOADED")
print("=" * 110)

print(
    f"\nFile:\n{FINAL_CANDIDATE_FILE}"
)

print(
    f"\nNumber of candidates: "
    f"{len(final_df):,}"
)

print(
    f"Number of columns: "
    f"{len(final_df.columns):,}"
)


# ============================================================================
# 3. BASIC QUALITY CONTROL
# ============================================================================

print("\n")
print("=" * 110)
print("QUALITY CONTROL")
print("=" * 110)


qc_results = {}

qc_results["Total candidates"] = len(final_df)

qc_results["Duplicate SMILES"] = (
    final_df["SMILES"]
    .duplicated()
    .sum()
)

qc_results["Missing SMILES"] = (
    final_df["SMILES"]
    .isna()
    .sum()
)

qc_results["Missing CNP_ID"] = (
    final_df["CNP_ID"]
    .isna()
    .sum()
)

qc_results["Missing COCONUT_ID"] = (
    final_df["COCONUT_ID"]
    .isna()
    .sum()
)


# Check RDKit validity

valid_structure_count = 0

for smiles in final_df["SMILES"]:

    if pd.notna(smiles):

        mol = Chem.MolFromSmiles(
            str(smiles)
        )

        if mol is not None:
            valid_structure_count += 1


qc_results[
    "Valid RDKit structures"
] = valid_structure_count

qc_results[
    "Invalid RDKit structures"
] = (
    len(final_df)
    - valid_structure_count
)


qc_df = pd.DataFrame(
    list(qc_results.items()),
    columns=[
        "QC_Metric",
        "Value"
    ]
)


qc_file = os.path.join(
    QC_DIR,
    "final_candidates_quality_control.csv"
)

qc_df.to_csv(
    qc_file,
    index=False
)


print(
    qc_df.to_string(index=False)
)

print(
    f"\n✓ QC saved:\n{qc_file}"
)


# ============================================================================
# 4. PREPARE RDKit MOLECULES
# ============================================================================

final_df["Molecule"] = final_df[
    "SMILES"
].apply(
    lambda x:
        Chem.MolFromSmiles(str(x))
        if pd.notna(x)
        else None
)

valid_mask = final_df[
    "Molecule"
].notna()

analysis_df = final_df[
    valid_mask
].copy().reset_index(drop=True)


print(
    f"\nValid molecules available for RDKit analysis: "
    f"{len(analysis_df):,}"
)


# ============================================================================
# 5. MOLECULAR DESCRIPTORS
# ============================================================================

print("\n")
print("=" * 110)
print("MOLECULAR DESCRIPTOR ANALYSIS")
print("=" * 110)


descriptor_rows = []


for _, row in analysis_df.iterrows():

    mol = row["Molecule"]

    descriptor_rows.append({

        "SDF_Index":
            row["SDF_Index"],

        "CNP_ID":
            row["CNP_ID"],

        "COCONUT_ID":
            row["COCONUT_ID"],

        "SMILES":
            row["SMILES"],

        "Molecular_Weight":
            Descriptors.MolWt(mol),

        "LogP":
            Crippen.MolLogP(mol),

        "TPSA":
            rdMolDescriptors.CalcTPSA(mol),

        "HBD":
            Lipinski.NumHDonors(mol),

        "HBA":
            Lipinski.NumHAcceptors(mol),

        "Rotatable_Bonds":
            Lipinski.NumRotatableBonds(mol),

        "Heavy_Atom_Count":
            Lipinski.HeavyAtomCount(mol),

        "Ring_Count":
            rdMolDescriptors.CalcNumRings(mol),

        "Aromatic_Ring_Count":
            rdMolDescriptors.CalcNumAromaticRings(mol),

        "Fraction_CSP3":
            rdMolDescriptors.CalcFractionCSP3(mol),

        "Formal_Charge":
            Chem.GetFormalCharge(mol),

        "QED":
            QED.qed(mol)

    })


descriptor_df = pd.DataFrame(
    descriptor_rows
)


descriptor_file = os.path.join(
    DESCRIPTOR_DIR,
    "final_candidates_molecular_descriptors.csv"
)

descriptor_df.to_csv(
    descriptor_file,
    index=False
)


print(
    descriptor_df[
        [
            "CNP_ID",
            "Molecular_Weight",
            "LogP",
            "TPSA",
            "HBD",
            "HBA",
            "Rotatable_Bonds",
            "Fraction_CSP3",
            "QED"
        ]
    ].to_string(
        index=False,
        float_format=lambda x: f"{x:.2f}"
    )
)

print(
    f"\n✓ Molecular descriptors saved:\n"
    f"{descriptor_file}"
)


# ============================================================================
# 6. DESCRIPTOR SUMMARY
# ============================================================================

descriptor_columns = [
    "Molecular_Weight",
    "LogP",
    "TPSA",
    "HBD",
    "HBA",
    "Rotatable_Bonds",
    "Heavy_Atom_Count",
    "Ring_Count",
    "Aromatic_Ring_Count",
    "Fraction_CSP3",
    "Formal_Charge",
    "QED"
]


descriptor_summary = (
    descriptor_df[
        descriptor_columns
    ]
    .describe()
    .T
)

descriptor_summary_file = os.path.join(
    DESCRIPTOR_DIR,
    "descriptor_summary_statistics.csv"
)

descriptor_summary.to_csv(
    descriptor_summary_file
)

print(
    f"✓ Descriptor summary saved:\n"
    f"{descriptor_summary_file}"
)


# ============================================================================
# 7. LIPINSKI RULE-OF-FIVE
# ============================================================================

print("\n")
print("=" * 110)
print("LIPINSKI RULE-OF-FIVE ANALYSIS")
print("=" * 110)


lipinski_df = descriptor_df.copy()


lipinski_df[
    "MW_OK"
] = lipinski_df[
    "Molecular_Weight"
] <= 500


lipinski_df[
    "LogP_OK"
] = lipinski_df[
    "LogP"
] <= 5


lipinski_df[
    "HBD_OK"
] = lipinski_df[
    "HBD"
] <= 5


lipinski_df[
    "HBA_OK"
] = lipinski_df[
    "HBA"
] <= 10


lipinski_df[
    "Lipinski_Rule_Count"
] = (
    lipinski_df[
        [
            "MW_OK",
            "LogP_OK",
            "HBD_OK",
            "HBA_OK"
        ]
    ]
    .sum(axis=1)
)


lipinski_df[
    "Lipinski_All_4"
] = (
    lipinski_df[
        "Lipinski_Rule_Count"
    ] == 4
)


lipinski_file = os.path.join(
    LIPINSKI_DIR,
    "final_candidates_lipinski_analysis.csv"
)

lipinski_df.to_csv(
    lipinski_file,
    index=False
)


lipinski_summary = pd.DataFrame({

    "Category": [
        "All 4 Lipinski criteria",
        "3 of 4 criteria",
        "2 of 4 criteria",
        "1 of 4 criteria",
        "0 of 4 criteria"
    ],

    "Number_of_Candidates": [
        (lipinski_df["Lipinski_Rule_Count"] == 4).sum(),
        (lipinski_df["Lipinski_Rule_Count"] == 3).sum(),
        (lipinski_df["Lipinski_Rule_Count"] == 2).sum(),
        (lipinski_df["Lipinski_Rule_Count"] == 1).sum(),
        (lipinski_df["Lipinski_Rule_Count"] == 0).sum()
    ]
})


lipinski_summary_file = os.path.join(
    LIPINSKI_DIR,
    "lipinski_summary.csv"
)

lipinski_summary.to_csv(
    lipinski_summary_file,
    index=False
)


print(
    lipinski_summary.to_string(
        index=False
    )
)

print(
    "\nNOTE: Lipinski analysis is descriptive."
)

print(
    "No candidate was removed because of Lipinski violations."
)

print(
    f"\n✓ Lipinski results saved:\n"
    f"{lipinski_file}"
)


# ============================================================================
# 8. PAINS ANALYSIS
# ============================================================================

print("\n")
print("=" * 110)
print("PAINS ANALYSIS")
print("=" * 110)


params = FilterCatalogParams()

params.AddCatalog(
    FilterCatalogParams.FilterCatalogs.PAINS
)

pains_catalog = FilterCatalog(
    params
)


pains_rows = []


for _, row in analysis_df.iterrows():

    mol = row["Molecule"]

    matches = pains_catalog.GetMatches(mol)

    pains_names = [
        match.GetDescription()
        for match in matches
    ]

    pains_rows.append({

        "SDF_Index":
            row["SDF_Index"],

        "CNP_ID":
            row["CNP_ID"],

        "COCONUT_ID":
            row["COCONUT_ID"],

        "SMILES":
            row["SMILES"],

        "PAINS_Positive":
            len(matches) > 0,

        "PAINS_Match_Count":
            len(matches),

        "PAINS_Matches":
            "; ".join(pains_names)
            if pains_names
            else ""

    })


pains_df = pd.DataFrame(
    pains_rows
)


pains_file = os.path.join(
    PAINS_DIR,
    "final_candidates_pains_analysis.csv"
)

pains_df.to_csv(
    pains_file,
    index=False
)


pains_summary = pd.DataFrame({

    "Category": [
        "PAINS positive",
        "PAINS negative"
    ],

    "Number_of_Candidates": [
        pains_df["PAINS_Positive"].sum(),
        (~pains_df["PAINS_Positive"]).sum()
    ]
})


pains_summary_file = os.path.join(
    PAINS_DIR,
    "pains_summary.csv"
)

pains_summary.to_csv(
    pains_summary_file,
    index=False
)


print(
    pains_summary.to_string(
        index=False
    )
)

print(
    f"\n✓ PAINS results saved:\n"
    f"{pains_file}"
)


# ============================================================================
# 9. MORGAN vs MACCS MODEL COMPARISON
# ============================================================================

print("\n")
print("=" * 110)
print("MORGAN vs MACCS MODEL COMPARISON")
print("=" * 110)


comparison_columns = [
    "SDF_Index",
    "CNP_ID",
    "COCONUT_ID",
    "SMILES",
    "Selected_By",
    "Morgan_Rank",
    "Morgan_Active_Probability",
    "MACCS_Rank",
    "MACCS_Active_Probability",
    "Mean_Active_Probability",
    "Min_Active_Probability"
]


comparison_columns = [
    col
    for col in comparison_columns
    if col in final_df.columns
]


model_comparison_df = final_df[
    comparison_columns
].copy()


comparison_file = os.path.join(
    MODEL_COMPARISON_DIR,
    "morgan_maccs_final_candidate_comparison.csv"
)

model_comparison_df.to_csv(
    comparison_file,
    index=False
)


# Selection source summary

selection_summary = (
    final_df[
        "Selected_By"
    ]
    .value_counts()
    .rename_axis("Selected_By")
    .reset_index(
        name="Number_of_Candidates"
    )
)


selection_summary_file = os.path.join(
    MODEL_COMPARISON_DIR,
    "selection_source_summary.csv"
)

selection_summary.to_csv(
    selection_summary_file,
    index=False
)


print(
    selection_summary.to_string(
        index=False
    )
)

print(
    f"\n✓ Model comparison saved:\n"
    f"{comparison_file}"
)


# ============================================================================
# 10. CHEMICAL DIVERSITY ANALYSIS
# ============================================================================

print("\n")
print("=" * 110)
print("CHEMICAL DIVERSITY ANALYSIS")
print("=" * 110)


# Generate Morgan fingerprints for final candidates

morgan_generator = (
    rdFingerprintGenerator.GetMorganGenerator(
        radius=3,
        fpSize=2048
    )
)


candidate_fps = [
    morgan_generator.GetFingerprint(
        mol
    )
    for mol in analysis_df["Molecule"]
]


n_candidates = len(candidate_fps)


# Pairwise similarity matrix

similarity_matrix = np.zeros(
    (
        n_candidates,
        n_candidates
    )
)


for i in range(n_candidates):

    similarity_matrix[i, i] = 1.0

    if i < n_candidates - 1:

        similarities = BulkTanimotoSimilarity(
            candidate_fps[i],
            candidate_fps[i + 1:]
        )

        for j, similarity in enumerate(
            similarities,
            start=i + 1
        ):

            similarity_matrix[
                i,
                j
            ] = similarity

            similarity_matrix[
                j,
                i
            ] = similarity


# Save similarity matrix

similarity_labels = analysis_df[
    "CNP_ID"
].astype(str).tolist()


similarity_matrix_df = pd.DataFrame(
    similarity_matrix,
    index=similarity_labels,
    columns=similarity_labels
)


similarity_matrix_file = os.path.join(
    DIVERSITY_DIR,
    "final_candidates_tanimoto_similarity_matrix.csv"
)

similarity_matrix_df.to_csv(
    similarity_matrix_file
)


# Extract unique pairwise similarities

pairwise_values = []

for i in range(n_candidates):

    for j in range(i + 1, n_candidates):

        pairwise_values.append({

            "CNP_ID_1":
                analysis_df.iloc[i]["CNP_ID"],

            "CNP_ID_2":
                analysis_df.iloc[j]["CNP_ID"],

            "Tanimoto_Similarity":
                similarity_matrix[i, j]

        })


pairwise_df = pd.DataFrame(
    pairwise_values
)


pairwise_file = os.path.join(
    DIVERSITY_DIR,
    "final_candidates_pairwise_tanimoto.csv"
)

pairwise_df.to_csv(
    pairwise_file,
    index=False
)


# Diversity summary

if len(pairwise_df) > 0:

    diversity_summary = pd.DataFrame({

        "Metric": [
            "Mean pairwise Tanimoto",
            "Median pairwise Tanimoto",
            "Maximum pairwise Tanimoto",
            "Minimum pairwise Tanimoto"
        ],

        "Value": [
            pairwise_df[
                "Tanimoto_Similarity"
            ].mean(),

            pairwise_df[
                "Tanimoto_Similarity"
            ].median(),

            pairwise_df[
                "Tanimoto_Similarity"
            ].max(),

            pairwise_df[
                "Tanimoto_Similarity"
            ].min()
        ]

    })

else:

    diversity_summary = pd.DataFrame()


diversity_summary_file = os.path.join(
    DIVERSITY_DIR,
    "chemical_diversity_summary.csv"
)

diversity_summary.to_csv(
    diversity_summary_file,
    index=False
)


print(
    diversity_summary.to_string(
        index=False,
        float_format=lambda x: f"{x:.4f}"
    )
)

print(
    f"\n✓ Chemical diversity analysis saved."
)


# ============================================================================
# 11. SCAFFOLD ANALYSIS
# ============================================================================

print("\n")
print("=" * 110)
print("SCAFFOLD ANALYSIS")
print("=" * 110)


scaffold_rows = []


for _, row in analysis_df.iterrows():

    mol = row["Molecule"]

    scaffold = MurckoScaffold.GetScaffoldForMol(
        mol
    )

    scaffold_smiles = Chem.MolToSmiles(
        scaffold,
        canonical=True
    )

    scaffold_rows.append({

        "CNP_ID":
            row["CNP_ID"],

        "COCONUT_ID":
            row["COCONUT_ID"],

        "SMILES":
            row["SMILES"],

        "Murcko_Scaffold_SMILES":
            scaffold_smiles

    })


scaffold_df = pd.DataFrame(
    scaffold_rows
)


scaffold_counts = (
    scaffold_df[
        "Murcko_Scaffold_SMILES"
    ]
    .value_counts()
    .rename_axis(
        "Murcko_Scaffold_SMILES"
    )
    .reset_index(
        name="Number_of_Candidates"
    )
)


scaffold_counts[
    "Scaffold_Rank"
] = np.arange(
    1,
    len(scaffold_counts) + 1
)


scaffold_file = os.path.join(
    SCAFFOLD_DIR,
    "candidate_murcko_scaffolds.csv"
)

scaffold_df.to_csv(
    scaffold_file,
    index=False
)


scaffold_counts_file = os.path.join(
    SCAFFOLD_DIR,
    "scaffold_frequency.csv"
)

scaffold_counts.to_csv(
    scaffold_counts_file,
    index=False
)


print(
    f"Unique Murcko scaffolds: "
    f"{len(scaffold_counts):,}"
)

print(
    "\nTop scaffolds:"
)

print(
    scaffold_counts.head(20).to_string(
        index=False
    )
)

print(
    f"\n✓ Scaffold analysis saved."
)


# ============================================================================
# 12. FIND KNOWN DPP4 COMPOUND DATASET
# ============================================================================

print("\n")
print("=" * 110)
print("SEARCHING FOR KNOWN DPP4 COMPOUND DATA")
print("=" * 110)


known_dpp4_file = None


possible_files = [
    "DPP4_compounds.csv",
    "bioactivity_data_raw.csv"
]


search_directories = [
    os.path.join(COCONUT_DIR, "1_input_data"),
    COCONUT_DIR
]


for directory in search_directories:

    for filename in possible_files:

        candidate_file = os.path.join(
            directory,
            filename
        )

        if os.path.exists(
            candidate_file
        ):

            known_dpp4_file = candidate_file

            break

    if known_dpp4_file is not None:
        break


if known_dpp4_file is None:

    print(
        "\n⚠ Known DPP4 dataset was not found."
    )

    print(
        "Similarity-to-known-DPP4 analysis and "
        "chemical-space comparison will be skipped."
    )

else:

    print(
        f"\nKnown DPP4 dataset found:\n"
        f"{known_dpp4_file}"
    )


# ============================================================================
# 13. SIMILARITY TO KNOWN DPP4 ACTIVES
# ============================================================================

if known_dpp4_file is not None:

    print("\n")
    print("=" * 110)
    print("SIMILARITY TO KNOWN DPP4 COMPOUNDS")
    print("=" * 110)

    known_df = pd.read_csv(
        known_dpp4_file
    )

    print(
        f"\nKnown dataset shape: "
        f"{known_df.shape}"
    )


    # Identify SMILES column

    smiles_candidates = [
        "canonical_smiles",
        "Canonical_SMILES",
        "SMILES",
        "smiles"
    ]

    known_smiles_column = None

    for col in smiles_candidates:

        if col in known_df.columns:

            known_smiles_column = col

            break


    if known_smiles_column is None:

        print(
            "\n⚠ No SMILES column found."
        )

    else:

        known_molecules = []

        for smiles in known_df[
            known_smiles_column
        ].dropna():

            mol = Chem.MolFromSmiles(
                str(smiles)
            )

            if mol is not None:

                known_molecules.append(
                    mol
                )


        known_fps = [
            morgan_generator.GetFingerprint(
                mol
            )
            for mol in known_molecules
        ]


        similarity_rows = []


        for idx, row in analysis_df.iterrows():

            candidate_fp = candidate_fps[idx]

            if len(known_fps) > 0:

                similarities = (
                    BulkTanimotoSimilarity(
                        candidate_fp,
                        known_fps
                    )
                )

                max_similarity = max(
                    similarities
                )

                mean_similarity = np.mean(
                    similarities
                )

                nearest_index = int(
                    np.argmax(
                        similarities
                    )
                )

            else:

                max_similarity = np.nan
                mean_similarity = np.nan
                nearest_index = None


            similarity_rows.append({

                "CNP_ID":
                    row["CNP_ID"],

                "COCONUT_ID":
                    row["COCONUT_ID"],

                "SMILES":
                    row["SMILES"],

                "Maximum_Tanimoto_to_Known_DPP4":
                    max_similarity,

                "Mean_Tanimoto_to_Known_DPP4":
                    mean_similarity,

                "Nearest_Known_DPP4_Index":
                    nearest_index

            })


        known_similarity_df = pd.DataFrame(
            similarity_rows
        )


        similarity_file = os.path.join(
            SIMILARITY_DIR,
            "similarity_to_known_dpp4_compounds.csv"
        )

        known_similarity_df.to_csv(
            similarity_file,
            index=False
        )


        print(
            known_similarity_df[
                [
                    "CNP_ID",
                    "Maximum_Tanimoto_to_Known_DPP4"
                ]
            ]
            .sort_values(
                "Maximum_Tanimoto_to_Known_DPP4",
                ascending=False
            )
            .head(20)
            .to_string(
                index=False,
                float_format=lambda x: f"{x:.4f}"
            )
        )


        print(
            f"\n✓ DPP4 similarity analysis saved:\n"
            f"{similarity_file}"
        )


# ============================================================================
# 14. CHEMICAL-SPACE PCA
# ============================================================================

if known_dpp4_file is not None and known_smiles_column is not None:

    print("\n")
    print("=" * 110)
    print("CHEMICAL-SPACE PCA")
    print("=" * 110)


    # Use up to 2,000 known compounds for visualization
    MAX_KNOWN_FOR_PCA = 2000


    known_mols_for_pca = known_molecules[
        :MAX_KNOWN_FOR_PCA
    ]


    known_fps_for_pca = [
        morgan_generator.GetFingerprint(
            mol
        )
        for mol in known_mols_for_pca
    ]


    all_fps = (
        known_fps_for_pca
        +
        candidate_fps
    )


    X_pca = np.zeros(
        (
            len(all_fps),
            2048
        ),
        dtype=np.float32
    )


    for i, fp in enumerate(all_fps):

        ConvertToNumpyArray(
            fp,
            X_pca[i]
        )


    pca = PCA(
        n_components=2,
        random_state=57
    )


    coordinates = pca.fit_transform(
        X_pca
    )


    n_known = len(
        known_fps_for_pca
    )


    pca_df = pd.DataFrame({

        "PC1":
            coordinates[:, 0],

        "PC2":
            coordinates[:, 1],

        "Dataset":
            (
                ["Known_DPP4"]
                * n_known
                +
                ["COCONUT_Final_Candidates"]
                * len(candidate_fps)
            )

    })


    pca_file = os.path.join(
        CHEMICAL_SPACE_DIR,
        "chemical_space_pca_coordinates.csv"
    )

    pca_df.to_csv(
        pca_file,
        index=False
    )


    # ------------------------------------------------------------------------
    # PCA plot
    # ------------------------------------------------------------------------

    plt.figure(
        figsize=(10, 8)
    )

    known_points = (
        pca_df[
            pca_df["Dataset"]
            == "Known_DPP4"
        ]
    )

    candidate_points = (
        pca_df[
            pca_df["Dataset"]
            == "COCONUT_Final_Candidates"
        ]
    )


    plt.scatter(
        known_points["PC1"],
        known_points["PC2"],
        alpha=0.35,
        s=20,
        label="Known DPP4 compounds"
    )


    plt.scatter(
        candidate_points["PC1"],
        candidate_points["PC2"],
        alpha=0.9,
        s=50,
        marker="x",
        label="COCONUT final candidates"
    )


    explained_1 = (
        pca.explained_variance_ratio_[0]
        * 100
    )

    explained_2 = (
        pca.explained_variance_ratio_[1]
        * 100
    )


    plt.xlabel(
        f"PC1 ({explained_1:.2f}% variance)"
    )

    plt.ylabel(
        f"PC2 ({explained_2:.2f}% variance)"
    )

    plt.title(
        "Chemical Space of Known DPP4 Compounds and COCONUT Candidates"
    )

    plt.legend()

    plt.tight_layout()


    pca_plot_file = os.path.join(
        CHEMICAL_SPACE_DIR,
        "chemical_space_pca.png"
    )

    plt.savefig(
        pca_plot_file,
        dpi=300,
        bbox_inches="tight"
    )

    plt.show()


    print(
        f"\n✓ PCA coordinates saved:\n"
        f"{pca_file}"
    )

    print(
        f"\n✓ PCA plot saved:\n"
        f"{pca_plot_file}"
    )


# ============================================================================
# 15. FINAL POST-SCREENING SUMMARY
# ============================================================================

print("\n")
print("=" * 110)
print("CREATING POST-SCREENING SUMMARY")
print("=" * 110)


summary_rows = [

    {
        "Analysis":
            "Final candidates",

        "Result":
            len(final_df)
    },

    {
        "Analysis":
            "Valid RDKit structures",

        "Result":
            valid_structure_count
    },

    {
        "Analysis":
            "Duplicate SMILES",

        "Result":
            final_df["SMILES"].duplicated().sum()
    },

    {
        "Analysis":
            "Morgan + MACCS candidates",

        "Result":
            (
                final_df["Selected_By"]
                .eq("Morgan + MACCS")
                .sum()
            )
            if "Selected_By" in final_df.columns
            else "Not available"
    },

    {
        "Analysis":
            "Morgan-only candidates",

        "Result":
            (
                final_df["Selected_By"]
                .eq("Morgan")
                .sum()
            )
            if "Selected_By" in final_df.columns
            else "Not available"
    },

    {
        "Analysis":
            "MACCS-only candidates",

        "Result":
            (
                final_df["Selected_By"]
                .eq("MACCS")
                .sum()
            )
            if "Selected_By" in final_df.columns
            else "Not available"
    },

    {
        "Analysis":
            "Unique Murcko scaffolds",

        "Result":
            len(scaffold_counts)
    },

    {
        "Analysis":
            "Lipinski 4/4",

        "Result":
            (
                lipinski_df[
                    "Lipinski_All_4"
                ].sum()
            )
    },

    {
        "Analysis":
            "PAINS positive",

        "Result":
            (
                pains_df[
                    "PAINS_Positive"
                ].sum()
            )
    }
]


post_summary_df = pd.DataFrame(
    summary_rows
)


post_summary_file = os.path.join(
    POST_SCREENING_DIR,
    "post_screening_summary.csv"
)

post_summary_df.to_csv(
    post_summary_file,
    index=False
)


# ============================================================================
# 16. FINAL TEXT REPORT
# ============================================================================

report_file = os.path.join(
    POST_SCREENING_DIR,
    "post_screening_report.txt"
)


with open(
    report_file,
    "w"
) as f:

    f.write(
        "COCONUT DPP4 POST-SCREENING ANALYSIS REPORT\n"
    )

    f.write(
        "=" * 90 + "\n\n"
    )

    f.write(
        "Input final candidate file:\n"
    )

    f.write(
        f"{FINAL_CANDIDATE_FILE}\n\n"
    )

    f.write(
        "FINAL CANDIDATE SELECTION\n"
    )

    f.write(
        "-" * 90 + "\n"
    )

    f.write(
        "Morgan Top 50 UNION MACCS Top 50\n"
    )

    f.write(
        "Duplicate molecules removed using canonical SMILES.\n"
    )

    f.write(
        "No additional probability cutoff was applied.\n"
    )

    f.write(
        "No artificial combined ranking was applied.\n\n"
    )


    f.write(
        "POST-SCREENING RESULTS\n"
    )

    f.write(
        "-" * 90 + "\n"
    )


    for _, row in post_summary_df.iterrows():

        f.write(
            f"{row['Analysis']:<35} : "
            f"{row['Result']}\n"
        )


    f.write(
        "\nANALYSES PERFORMED\n"
    )

    f.write(
        "-" * 90 + "\n"
    )

    f.write(
        "1. Final candidate quality control\n"
    )

    f.write(
        "2. Molecular descriptors\n"
    )

    f.write(
        "3. Lipinski Rule-of-Five characterization\n"
    )

    f.write(
        "4. PAINS analysis\n"
    )

    f.write(
        "5. Morgan vs MACCS comparison\n"
    )

    f.write(
        "6. Chemical diversity / Tanimoto similarity\n"
    )

    f.write(
        "7. Murcko scaffold analysis\n"
    )

    f.write(
        "8. Similarity to known DPP4 compounds\n"
    )

    f.write(
        "9. Chemical-space PCA\n"
    )


print(
    post_summary_df.to_string(
        index=False
    )
)


print(
    f"\n✓ Post-screening summary saved:\n"
    f"{post_summary_file}"
)

print(
    f"\n✓ Post-screening report saved:\n"
    f"{report_file}"
)


# ============================================================================
# 17. FINAL COMPLETION MESSAGE
# ============================================================================

print("\n")
print("=" * 110)
print("POST-SCREENING ANALYSIS COMPLETED")
print("=" * 110)

print(
    f"\nFinal candidates analyzed : "
    f"{len(final_df):,}"
)

print(
    f"\nAll post-screening results are saved in:"
    f"\n{POST_SCREENING_DIR}"
)

print("\n✓ Quality control")
print("✓ Molecular descriptors")
print("✓ Lipinski analysis")
print("✓ PAINS analysis")
print("✓ Morgan/MACCS comparison")
print("✓ Chemical diversity")
print("✓ Scaffold analysis")
print("✓ Similarity to known DPP4 compounds")
print("✓ Chemical-space PCA")
print("✓ Summary report")

print("\n" + "=" * 110)
print("POST-SCREENING ANALYSIS FINISHED SUCCESSFULLY")
print("=" * 110)

POST-SCREENING ANALYSIS DIRECTORIES READY

Main directory:
coconut_analysis/6_post_screening_analysis


FINAL CANDIDATES LOADED

File:
coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv

Number of candidates: 903
Number of columns: 20


QUALITY CONTROL
               QC_Metric  Value
        Total candidates    903
        Duplicate SMILES      0
          Missing SMILES      0
          Missing CNP_ID      0
      Missing COCONUT_ID      0
  Valid RDKit structures    903
Invalid RDKit structures      0

✓ QC saved:
coconut_analysis/6_post_screening_analysis/01_quality_control/final_candidates_quality_control.csv

Valid molecules available for RDKit analysis: 903


MOLECULAR DESCRIPTOR ANALYSIS
    CNP_ID  Molecular_Weight  LogP   TPSA  HBD  HBA  Rotatable_Bonds  Fraction_CSP3  QED
CNP0041910            371.48  4.05  38.13    0    4                3           0.33 0.70
CNP0247566            279.26 -1.68 139.54    4    9                2           0.36 0.51
CNP02475

In [18]:
# ============================================================================
# VIEW FINAL CANDIDATES — FIRST 5 ROWS
# ============================================================================

import os
import pandas as pd

INPUT_FILE = os.path.join(
    "coconut_analysis",
    "5_final_candidates",
    "coconut_final_unique_candidates.csv"
)

# Load final candidates
final_df = pd.read_csv(INPUT_FILE)

print("=" * 120)
print("FINAL COCONUT CANDIDATES — FIRST 5 ROWS")
print("=" * 120)

display(final_df.head(5))

print("\n" + "=" * 120)
print("COLUMN NAMES")
print("=" * 120)

for i, col in enumerate(final_df.columns, start=1):
    print(f"{i:3d}. {col}")

print("\nShape:", final_df.shape)

FINAL COCONUT CANDIDATES — FIRST 5 ROWS


,SDF_Index,CNP_ID,COCONUT_ID,SMILES,Selected_By,Morgan_Rank,Morgan_Prediction,Morgan_Active_Probability,MACCS_Rank,MACCS_Prediction,MACCS_Active_Probability,Mean_Active_Probability,Min_Active_Probability,SDF_Index_Morgan,CNP_ID_Morgan,COCONUT_ID_Morgan,SDF_Index_MACCS,CNP_ID_MACCS,COCONUT_ID_MACCS,COCONUT_IDENTIFIER
0,3382.0,CNP0041910,CNP0041910,C/C=C/c1ccc(=O)n2c1[C@@H]1C[C@@H](CN(Cc3cnc4cc...,Morgan,259.0,1.0,0.607135,NaN,NaN,NaN,0.607135,0.607135,3382.0,CNP0041910,CNP0041910,NaN,NaN,NaN,CNP0041910.1
1,61511.0,CNP0247566,CNP0247566,C=C1O[C@@](CO)(n2cnc3c(N)ncnc32)[C@@H](O)[C@H]1O,MACCS,NaN,NaN,NaN,203.0,1.0,0.775919,0.775919,0.775919,NaN,NaN,NaN,61511.0,CNP0247566,CNP0247566,CNP0247566.2
2,179242.0,CNP0247566,CNP0247566,C=C1O[C@@](CO)(n2cnc3c(N)ncnc32)[C@H](O)[C@@H]1O,MACCS,NaN,NaN,NaN,205.0,1.0,0.775919,0.775919,0.775919,NaN,NaN,NaN,179242.0,CNP0247566,CNP0247566,CNP0247566.1
3,78250.0,CNP0247566,CNP0247566,C=C1O[C@](CO)(n2cnc3c(N)ncnc32)[C@@H](O)[C@@H]1O,MACCS,NaN,NaN,NaN,202.0,1.0,0.775919,0.775919,0.775919,NaN,NaN,NaN,78250.0,CNP0247566,CNP0247566,CNP0247566.3
4,56881.0,CNP0247566,CNP0247566,C=C1O[C@](CO)(n2cnc3c(N)ncnc32)[C@@H](O)[C@H]1O,MACCS,NaN,NaN,NaN,204.0,1.0,0.775919,0.775919,0.775919,NaN,NaN,NaN,56881.0,CNP0247566,CNP0247566,CNP0247566.6



COLUMN NAMES
  1. SDF_Index
  2. CNP_ID
  3. COCONUT_ID
  4. SMILES
  5. Selected_By
  6. Morgan_Rank
  7. Morgan_Prediction
  8. Morgan_Active_Probability
  9. MACCS_Rank
 10. MACCS_Prediction
 11. MACCS_Active_Probability
 12. Mean_Active_Probability
 13. Min_Active_Probability
 14. SDF_Index_Morgan
 15. CNP_ID_Morgan
 16. COCONUT_ID_Morgan
 17. SDF_Index_MACCS
 18. CNP_ID_MACCS
 19. COCONUT_ID_MACCS
 20. COCONUT_IDENTIFIER

Shape: (903, 20)


In [19]:
# ============================================================================
# CALCULATE RDKit NP-LIKENESS SCORE FOR FINAL COCONUT CANDIDATES
# ============================================================================
#
# Input:
#   coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv
#
# Output:
#   coconut_analysis/5_final_candidates/coconut_candidates_with_np_score.csv
#
# NP score:
#   RDKit Contrib/NP_Score implementation
#   Approximate range: -5 to +5
#
# ============================================================================

import os
import sys
import pandas as pd
from rdkit import Chem


# ============================================================================
# 1. SETTINGS
# ============================================================================

INPUT_CSV = "coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv"

OUTPUT_CSV = "coconut_analysis/5_final_candidates/coconut_candidates_with_np_score.csv"


# ============================================================================
# 2. LOAD RDKit NP_Score
# ============================================================================

contrib_path = os.path.join(
    os.environ["CONDA_PREFIX"],
    "share",
    "RDKit",
    "Contrib"
)

if contrib_path not in sys.path:
    sys.path.append(contrib_path)

from NP_Score import npscorer

print("=" * 80)
print("RDKit NP-LIKENESS SCORE CALCULATION")
print("=" * 80)

print(f"RDKit Contrib path : {contrib_path}")


# ============================================================================
# 3. LOAD NP SCORE MODEL
# ============================================================================

fscore = npscorer.readNPModel()

print("✓ NP_Score model loaded successfully")


# ============================================================================
# 4. LOAD FINAL CANDIDATES
# ============================================================================

df = pd.read_csv(INPUT_CSV)

print(f"\nInput file        : {INPUT_CSV}")
print(f"Number of rows    : {len(df)}")

print("\nColumns available:")
print(df.columns.tolist())


# ============================================================================
# 5. AUTOMATICALLY IDENTIFY SMILES COLUMN
# ============================================================================

possible_smiles_columns = [
    "canonical_smiles",
    "Canonical_SMILES",
    "canonical_SMILES",
    "SMILES",
    "smiles",
    "Smiles"
]

smiles_column = None

for col in possible_smiles_columns:
    if col in df.columns:
        smiles_column = col
        break

if smiles_column is None:
    raise ValueError(
        "No SMILES column was found.\n"
        "Please check the column names printed above."
    )

print(f"\nSMILES column     : {smiles_column}")


# ============================================================================
# 6. CALCULATE NP SCORE
# ============================================================================

np_scores = []
valid_structures = 0
invalid_structures = 0

for smiles in df[smiles_column]:

    if pd.isna(smiles):
        np_scores.append(None)
        invalid_structures += 1
        continue

    mol = Chem.MolFromSmiles(str(smiles))

    if mol is None:
        np_scores.append(None)
        invalid_structures += 1
        continue

    try:
        score = npscorer.scoreMol(mol, fscore)
        np_scores.append(score)
        valid_structures += 1

    except Exception:
        np_scores.append(None)
        invalid_structures += 1


# ============================================================================
# 7. ADD NP SCORE TO DATAFRAME
# ============================================================================

df["NP_Score"] = np_scores


# ============================================================================
# 8. SAVE RESULT
# ============================================================================

df.to_csv(OUTPUT_CSV, index=False)


# ============================================================================
# 9. SUMMARY
# ============================================================================

print("\n" + "=" * 80)
print("NP SCORE CALCULATION COMPLETED")
print("=" * 80)

print(f"Total candidates       : {len(df)}")
print(f"Valid structures       : {valid_structures}")
print(f"Invalid structures     : {invalid_structures}")

if valid_structures > 0:

    valid_scores = df["NP_Score"].dropna()

    print(f"\nMinimum NP Score       : {valid_scores.min():.3f}")
    print(f"Maximum NP Score       : {valid_scores.max():.3f}")
    print(f"Mean NP Score          : {valid_scores.mean():.3f}")
    print(f"Median NP Score        : {valid_scores.median():.3f}")


print(f"\nOutput file:")
print(OUTPUT_CSV)


# ============================================================================
# 10. SHOW FIRST 5 CANDIDATES
# ============================================================================

print("\n" + "=" * 80)
print("FIRST 5 CANDIDATES WITH NP SCORE")
print("=" * 80)

display(df.head(5))

RDKit NP-LIKENESS SCORE CALCULATION
RDKit Contrib path : /home/phytrc/miniconda3/envs/aidd/share/RDKit/Contrib
✓ NP_Score model loaded successfully

Input file        : coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv
Number of rows    : 903

Columns available:
['SDF_Index', 'CNP_ID', 'COCONUT_ID', 'SMILES', 'Selected_By', 'Morgan_Rank', 'Morgan_Prediction', 'Morgan_Active_Probability', 'MACCS_Rank', 'MACCS_Prediction', 'MACCS_Active_Probability', 'Mean_Active_Probability', 'Min_Active_Probability', 'SDF_Index_Morgan', 'CNP_ID_Morgan', 'COCONUT_ID_Morgan', 'SDF_Index_MACCS', 'CNP_ID_MACCS', 'COCONUT_ID_MACCS', 'COCONUT_IDENTIFIER']

SMILES column     : SMILES

NP SCORE CALCULATION COMPLETED
Total candidates       : 903
Valid structures       : 903
Invalid structures     : 0

Minimum NP Score       : -2.756
Maximum NP Score       : 2.063
Mean NP Score          : -1.025
Median NP Score        : -1.307

Output file:
coconut_analysis/5_final_candidates/coconut_candid

reading NP model ...
model in


,SDF_Index,CNP_ID,COCONUT_ID,SMILES,Selected_By,Morgan_Rank,Morgan_Prediction,Morgan_Active_Probability,MACCS_Rank,MACCS_Prediction,...,Mean_Active_Probability,Min_Active_Probability,SDF_Index_Morgan,CNP_ID_Morgan,COCONUT_ID_Morgan,SDF_Index_MACCS,CNP_ID_MACCS,COCONUT_ID_MACCS,COCONUT_IDENTIFIER,NP_Score
0,3382.0,CNP0041910,CNP0041910,C/C=C/c1ccc(=O)n2c1[C@@H]1C[C@@H](CN(Cc3cnc4cc...,Morgan,259.0,1.0,0.607135,NaN,NaN,...,0.607135,0.607135,3382.0,CNP0041910,CNP0041910,NaN,NaN,NaN,CNP0041910.1,-0.661522
1,61511.0,CNP0247566,CNP0247566,C=C1O[C@@](CO)(n2cnc3c(N)ncnc32)[C@@H](O)[C@H]1O,MACCS,NaN,NaN,NaN,203.0,1.0,...,0.775919,0.775919,NaN,NaN,NaN,61511.0,CNP0247566,CNP0247566,CNP0247566.2,0.788921
2,179242.0,CNP0247566,CNP0247566,C=C1O[C@@](CO)(n2cnc3c(N)ncnc32)[C@H](O)[C@@H]1O,MACCS,NaN,NaN,NaN,205.0,1.0,...,0.775919,0.775919,NaN,NaN,NaN,179242.0,CNP0247566,CNP0247566,CNP0247566.1,0.788921
3,78250.0,CNP0247566,CNP0247566,C=C1O[C@](CO)(n2cnc3c(N)ncnc32)[C@@H](O)[C@@H]1O,MACCS,NaN,NaN,NaN,202.0,1.0,...,0.775919,0.775919,NaN,NaN,NaN,78250.0,CNP0247566,CNP0247566,CNP0247566.3,0.788921
4,56881.0,CNP0247566,CNP0247566,C=C1O[C@](CO)(n2cnc3c(N)ncnc32)[C@@H](O)[C@H]1O,MACCS,NaN,NaN,NaN,204.0,1.0,...,0.775919,0.775919,NaN,NaN,NaN,56881.0,CNP0247566,CNP0247566,CNP0247566.6,0.788921


In [20]:
# ============================================================================
# CALCULATE AND RANK RDKit NP-LIKENESS SCORE
# FOR FINAL COCONUT CANDIDATES
# ============================================================================
#
# Input:
#   coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv
#
# Output:
#   coconut_analysis/5_final_candidates/coconut_candidates_with_np_score.csv
#
# Ranking:
#   Highest NP_Score → Lowest NP_Score
#
# NP score:
#   RDKit Contrib/NP_Score implementation
#   Approximate range: -5 to +5
#
# ============================================================================

import os
import sys
import pandas as pd
from rdkit import Chem


# ============================================================================
# 1. SETTINGS
# ============================================================================

INPUT_CSV = (
    "coconut_analysis/5_final_candidates/"
    "coconut_final_unique_candidates.csv"
)

OUTPUT_CSV = (
    "coconut_analysis/5_final_candidates/"
    "coconut_candidates_with_np_score.csv"
)


# ============================================================================
# 2. LOAD RDKit NP_Score
# ============================================================================

contrib_path = os.path.join(
    os.environ["CONDA_PREFIX"],
    "share",
    "RDKit",
    "Contrib"
)

if contrib_path not in sys.path:
    sys.path.append(contrib_path)

from NP_Score import npscorer


print("=" * 100)
print("RDKit NP-LIKENESS SCORE CALCULATION AND RANKING")
print("=" * 100)

print(
    f"RDKit Contrib path : {contrib_path}"
)


# ============================================================================
# 3. LOAD NP SCORE MODEL
# ============================================================================

fscore = npscorer.readNPModel()

print(
    "✓ NP_Score model loaded successfully"
)


# ============================================================================
# 4. LOAD FINAL CANDIDATES
# ============================================================================

df = pd.read_csv(
    INPUT_CSV
)

print(
    f"\nInput file        : {INPUT_CSV}"
)

print(
    f"Number of rows    : {len(df):,}"
)

print(
    "\nColumns available:"
)

print(
    df.columns.tolist()
)


# ============================================================================
# 5. AUTOMATICALLY IDENTIFY SMILES COLUMN
# ============================================================================

possible_smiles_columns = [

    "canonical_smiles",

    "Canonical_SMILES",

    "canonical_SMILES",

    "SMILES",

    "smiles",

    "Smiles"
]


smiles_column = None


for col in possible_smiles_columns:

    if col in df.columns:

        smiles_column = col

        break


if smiles_column is None:

    raise ValueError(
        "No SMILES column was found.\n"
        "Please check the column names printed above."
    )


print(
    f"\nSMILES column     : {smiles_column}"
)


# ============================================================================
# 6. CALCULATE NP SCORE
# ============================================================================

np_scores = []

valid_structures = 0

invalid_structures = 0


for smiles in df[smiles_column]:

    # ------------------------------------------------------------------------
    # Missing SMILES
    # ------------------------------------------------------------------------

    if pd.isna(smiles):

        np_scores.append(None)

        invalid_structures += 1

        continue


    # ------------------------------------------------------------------------
    # Convert SMILES → RDKit molecule
    # ------------------------------------------------------------------------

    mol = Chem.MolFromSmiles(
        str(smiles)
    )


    if mol is None:

        np_scores.append(None)

        invalid_structures += 1

        continue


    # ------------------------------------------------------------------------
    # Calculate NP score
    # ------------------------------------------------------------------------

    try:

        score = npscorer.scoreMol(
            mol,
            fscore
        )

        np_scores.append(
            float(score)
        )

        valid_structures += 1


    except Exception:

        np_scores.append(None)

        invalid_structures += 1


# ============================================================================
# 7. ADD NP SCORE
# ============================================================================

df["NP_Score"] = np_scores


# ============================================================================
# 8. SORT BY NP SCORE
# ============================================================================
#
# Highest NP_Score first.
#
# Molecules with missing NP_Score values are placed at the bottom.
#
# ============================================================================

df = (
    df
    .sort_values(
        by="NP_Score",
        ascending=False,
        na_position="last"
    )
    .reset_index(drop=True)
)


# ============================================================================
# 9. CREATE NP RANK
# ============================================================================
#
# Only molecules with a valid NP_Score receive a rank.
#
# ============================================================================

df["NP_Rank"] = pd.NA


valid_mask = df["NP_Score"].notna()


df.loc[
    valid_mask,
    "NP_Rank"
] = range(
    1,
    valid_mask.sum() + 1
)


# ============================================================================
# 10. REORDER COLUMNS
# ============================================================================
#
# Put NP_Rank and NP_Score near the beginning for easy inspection.
#
# ============================================================================

priority_columns = [

    "NP_Rank",

    "NP_Score",

    "SDF_Index",

    "CNP_ID",

    "COCONUT_ID",

    "SMILES"
]


priority_columns = [
    col
    for col in priority_columns
    if col in df.columns
]


remaining_columns = [
    col
    for col in df.columns
    if col not in priority_columns
]


df = df[
    priority_columns +
    remaining_columns
]


# ============================================================================
# 11. SAVE SORTED RESULT
# ============================================================================

df.to_csv(
    OUTPUT_CSV,
    index=False
)


# ============================================================================
# 12. SUMMARY
# ============================================================================

print("\n" + "=" * 100)
print("NP SCORE CALCULATION AND RANKING COMPLETED")
print("=" * 100)

print(
    f"Total candidates       : {len(df):,}"
)

print(
    f"Valid structures       : {valid_structures:,}"
)

print(
    f"Invalid structures     : {invalid_structures:,}"
)


if valid_structures > 0:

    valid_scores = (
        df["NP_Score"]
        .dropna()
    )

    print(
        f"\nMinimum NP Score       : "
        f"{valid_scores.min():.3f}"
    )

    print(
        f"Maximum NP Score       : "
        f"{valid_scores.max():.3f}"
    )

    print(
        f"Mean NP Score          : "
        f"{valid_scores.mean():.3f}"
    )

    print(
        f"Median NP Score        : "
        f"{valid_scores.median():.3f}"
    )


print(
    f"\nOutput file:"
)

print(
    OUTPUT_CSV
)


# ============================================================================
# 13. SHOW TOP 5 NP-LIKE CANDIDATES
# ============================================================================

print("\n" + "=" * 100)
print("TOP 5 CANDIDATES BY NP-LIKENESS SCORE")
print("=" * 100)


display(
    df.head(5)
)

RDKit NP-LIKENESS SCORE CALCULATION AND RANKING
RDKit Contrib path : /home/phytrc/miniconda3/envs/aidd/share/RDKit/Contrib
✓ NP_Score model loaded successfully

Input file        : coconut_analysis/5_final_candidates/coconut_final_unique_candidates.csv
Number of rows    : 903

Columns available:
['SDF_Index', 'CNP_ID', 'COCONUT_ID', 'SMILES', 'Selected_By', 'Morgan_Rank', 'Morgan_Prediction', 'Morgan_Active_Probability', 'MACCS_Rank', 'MACCS_Prediction', 'MACCS_Active_Probability', 'Mean_Active_Probability', 'Min_Active_Probability', 'SDF_Index_Morgan', 'CNP_ID_Morgan', 'COCONUT_ID_Morgan', 'SDF_Index_MACCS', 'CNP_ID_MACCS', 'COCONUT_ID_MACCS', 'COCONUT_IDENTIFIER']

SMILES column     : SMILES

NP SCORE CALCULATION AND RANKING COMPLETED
Total candidates       : 903
Valid structures       : 903
Invalid structures     : 0

Minimum NP Score       : -2.756
Maximum NP Score       : 2.063
Mean NP Score          : -1.025
Median NP Score        : -1.307

Output file:
coconut_analysis/5_final_c

reading NP model ...
model in


,NP_Rank,NP_Score,SDF_Index,CNP_ID,COCONUT_ID,SMILES,Selected_By,Morgan_Rank,Morgan_Prediction,Morgan_Active_Probability,...,MACCS_Active_Probability,Mean_Active_Probability,Min_Active_Probability,SDF_Index_Morgan,CNP_ID_Morgan,COCONUT_ID_Morgan,SDF_Index_MACCS,CNP_ID_MACCS,COCONUT_ID_MACCS,COCONUT_IDENTIFIER
0,1,2.062998,100561.0,CNP0427097,CNP0427097,CO[C@@H]1[C@@H]2O[C@@]3(O)[C@H](O)[C@H](O)[C@@...,Morgan,397.0,1.0,0.591778,...,NaN,0.591778,0.591778,100561.0,CNP0427097,CNP0427097,NaN,NaN,NaN,CNP0427097.1
1,2,1.983379,30264.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@@H](n4cnc5c(N)...,Morgan,300.0,1.0,0.601835,...,NaN,0.601835,0.601835,30264.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.3
2,3,1.983379,174849.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@@H](n4cnc5c(N)...,Morgan,297.0,1.0,0.601835,...,NaN,0.601835,0.601835,174849.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.1
3,4,1.983379,170361.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@H](n4cnc5c(N)n...,Morgan,296.0,1.0,0.601835,...,NaN,0.601835,0.601835,170361.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.7
4,5,1.983379,123350.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@@H](n4cnc5c(N)...,Morgan,299.0,1.0,0.601835,...,NaN,0.601835,0.601835,123350.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.6


In [21]:
# ============================================================================
# CREATE CSV WITH POSITIVE NP SCORE ONLY
# ============================================================================
#
# Input:
#   coconut_analysis/5_final_candidates/coconut_candidates_with_np_score.csv
#
# Output:
#   coconut_analysis/5_final_candidates/coconut_candidates_positive_np_score.csv
#
# Selection:
#   NP_Score > 0
#
# ============================================================================

import pandas as pd


# ============================================================================
# 1. SETTINGS
# ============================================================================

INPUT_CSV = (
    "coconut_analysis/5_final_candidates/"
    "coconut_candidates_with_np_score.csv"
)

OUTPUT_CSV = (
    "coconut_analysis/5_final_candidates/"
    "coconut_candidates_positive_np_score.csv"
)


# ============================================================================
# 2. LOAD NP-SCORE RESULTS
# ============================================================================

df = pd.read_csv(INPUT_CSV)

print("=" * 100)
print("FILTERING CANDIDATES WITH POSITIVE NP SCORE")
print("=" * 100)

print(
    f"Input file          : {INPUT_CSV}"
)

print(
    f"Total candidates    : {len(df):,}"
)


# ============================================================================
# 3. FILTER POSITIVE NP SCORE
# ============================================================================
#
# Keep only molecules with:
#
#       NP_Score > 0
#
# ============================================================================

positive_np_df = (
    df[
        df["NP_Score"] > 0
    ]
    .copy()
    .reset_index(drop=True)
)


# ============================================================================
# 4. RESTORE NP RANK
# ============================================================================
#
# Re-rank the positive-NP-score molecules from highest to lowest.
#
# ============================================================================

positive_np_df = (
    positive_np_df
    .sort_values(
        by="NP_Score",
        ascending=False
    )
    .reset_index(drop=True)
)

positive_np_df["NP_Rank"] = range(
    1,
    len(positive_np_df) + 1
)


# ============================================================================
# 5. SAVE NEW CSV
# ============================================================================

positive_np_df.to_csv(
    OUTPUT_CSV,
    index=False
)


# ============================================================================
# 6. SUMMARY
# ============================================================================

print("\n" + "=" * 100)
print("POSITIVE NP SCORE FILTERING COMPLETED")
print("=" * 100)

print(
    f"Original candidates       : "
    f"{len(df):,}"
)

print(
    f"Positive NP_Score (>0)    : "
    f"{len(positive_np_df):,}"
)

print(
    f"Removed (NP_Score <= 0)   : "
    f"{len(df) - len(positive_np_df):,}"
)


if len(positive_np_df) > 0:

    print(
        f"\nMinimum positive NP_Score : "
        f"{positive_np_df['NP_Score'].min():.3f}"
    )

    print(
        f"Maximum NP_Score          : "
        f"{positive_np_df['NP_Score'].max():.3f}"
    )

    print(
        f"Mean NP_Score             : "
        f"{positive_np_df['NP_Score'].mean():.3f}"
    )


print(
    f"\nOutput file:"
)

print(
    OUTPUT_CSV
)


# ============================================================================
# 7. SHOW FIRST 5
# ============================================================================

print("\n" + "=" * 100)
print("TOP 5 POSITIVE NP-SCORE CANDIDATES")
print("=" * 100)

display(
    positive_np_df.head(5)
)

FILTERING CANDIDATES WITH POSITIVE NP SCORE
Input file          : coconut_analysis/5_final_candidates/coconut_candidates_with_np_score.csv
Total candidates    : 903

POSITIVE NP SCORE FILTERING COMPLETED
Original candidates       : 903
Positive NP_Score (>0)    : 144
Removed (NP_Score <= 0)   : 759

Minimum positive NP_Score : 0.011
Maximum NP_Score          : 2.063
Mean NP_Score             : 0.930

Output file:
coconut_analysis/5_final_candidates/coconut_candidates_positive_np_score.csv

TOP 5 POSITIVE NP-SCORE CANDIDATES


,NP_Rank,NP_Score,SDF_Index,CNP_ID,COCONUT_ID,SMILES,Selected_By,Morgan_Rank,Morgan_Prediction,Morgan_Active_Probability,...,MACCS_Active_Probability,Mean_Active_Probability,Min_Active_Probability,SDF_Index_Morgan,CNP_ID_Morgan,COCONUT_ID_Morgan,SDF_Index_MACCS,CNP_ID_MACCS,COCONUT_ID_MACCS,COCONUT_IDENTIFIER
0,1,2.062998,100561.0,CNP0427097,CNP0427097,CO[C@@H]1[C@@H]2O[C@@]3(O)[C@H](O)[C@H](O)[C@@...,Morgan,397.0,1.0,0.591778,...,NaN,0.591778,0.591778,100561.0,CNP0427097,CNP0427097,NaN,NaN,NaN,CNP0427097.1
1,2,1.983379,30264.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@@H](n4cnc5c(N)...,Morgan,300.0,1.0,0.601835,...,NaN,0.601835,0.601835,30264.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.3
2,3,1.983379,174849.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@@H](n4cnc5c(N)...,Morgan,297.0,1.0,0.601835,...,NaN,0.601835,0.601835,174849.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.1
3,4,1.983379,170361.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@H](n4cnc5c(N)n...,Morgan,296.0,1.0,0.601835,...,NaN,0.601835,0.601835,170361.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.7
4,5,1.983379,123350.0,CNP0228105,CNP0228105,COC(=O)[C@H]1O[C@@H]2C[C@H]3O[C@@H](n4cnc5c(N)...,Morgan,299.0,1.0,0.601835,...,NaN,0.601835,0.601835,123350.0,CNP0228105,CNP0228105,NaN,NaN,NaN,CNP0228105.6


# Post-Screening Analysis of Final COCONUT Candidates

## 1. Purpose of the Post-Screening Analysis

After applying the finalized Morgan and MACCS machine-learning models to the complete COCONUT database, the top 50 compounds from each fingerprint-based screening workflow were selected.

The two Top-50 lists were then combined using a **UNION strategy**, and duplicate molecules were removed using canonical SMILES.

In the present screening:

* Morgan Top 50 = 50 compounds
* MACCS Top 50 = 50 compounds
* Morgan/MACCS overlap = 30 compounds
* Final unique candidates = **70 compounds**

Therefore:

**50 + 50 − 30 = 70 unique candidates**

The 70 compounds constitute the final ML-screened COCONUT candidate set.

The purpose of the post-screening analysis is **not to change this selection**, but to characterize, validate, compare, and prioritize the final candidates using additional chemical and structural information.

---

# 2. Important Methodological Principle

The final candidate selection was defined as:

**Morgan Top 50 UNION MACCS Top 50 → remove duplicate canonical SMILES**

No additional probability cutoff was applied after the Top-50 selection.

No artificial combined ranking was applied to the final union.

Therefore, the post-screening analyses should be considered **characterization and interpretation analyses**, rather than a hidden additional filtering step.

This distinction is important for maintaining a transparent and reproducible workflow.

---

# 3. Post-Screening Analyses Performed

The following analyses were performed:

1. Quality control
2. Molecular descriptor analysis
3. Lipinski Rule-of-Five analysis
4. PAINS analysis
5. Morgan versus MACCS comparison
6. Chemical diversity analysis
7. Scaffold analysis
8. Similarity to known DPP4 compounds
9. Chemical-space PCA
10. Overall post-screening summary

All results are stored in:

`coconut_analysis/6_post_screening_analysis/`

---

# 4. Quality Control

## Purpose

Quality control verifies that the final candidate set is chemically and computationally valid.

The analysis checks:

* Total number of candidates
* Duplicate canonical SMILES
* Missing SMILES
* Missing CNP IDs
* Missing COCONUT IDs
* Validity of RDKit molecular structures

## Expected interpretation

Ideally:

* All 70 candidates should have valid structures.
* No duplicate canonical SMILES should remain.
* Critical identifiers should be available.
* The final candidate table should be suitable for subsequent chemical analysis.

The quality-control results are stored in:

`01_quality_control/final_candidates_quality_control.csv`

## Scientific interpretation

A successful quality-control analysis confirms that the final candidate set is structurally usable and that duplicate compounds have not been unintentionally retained.

---

# 5. Molecular Descriptor Analysis

## Purpose

Molecular descriptors provide a basic chemical-property profile of the final COCONUT candidates.

The analysis calculates:

* Molecular weight (MW)
* LogP
* Topological polar surface area (TPSA)
* Hydrogen-bond donors (HBD)
* Hydrogen-bond acceptors (HBA)
* Rotatable bonds
* Heavy atom count
* Ring count
* Aromatic ring count
* Fraction sp3
* Formal charge
* QED

## Why this is useful

These descriptors help answer:

> What type of molecules were identified by the ML screening?

For example, molecular weight describes molecular size, LogP provides information about lipophilicity, TPSA provides information about polarity, and HBD/HBA describe hydrogen-bonding capacity.

Natural products can have substantially different physicochemical properties from conventional synthetic drug-like compounds. Therefore, these values should be interpreted in the context of natural-product chemical space.

## Important interpretation

The descriptor analysis is primarily **descriptive**.

A high molecular weight, high TPSA, or unusual LogP does not automatically mean that a candidate is unsuitable.

The descriptor distributions should be used to understand the chemical characteristics of the ML-selected candidates.

Results are stored in:

`02_molecular_descriptors/final_candidates_molecular_descriptors.csv`

and

`02_molecular_descriptors/descriptor_summary_statistics.csv`

---

# 6. Lipinski Rule-of-Five Analysis

## Purpose

Lipinski Rule-of-Five analysis provides a commonly used description of oral-drug-like physicochemical properties.

The criteria evaluated are:

* MW ≤ 500 Da
* LogP ≤ 5
* HBD ≤ 5
* HBA ≤ 10

The analysis records how many of the four criteria each candidate satisfies.

## Interpretation

Candidates can be classified as satisfying:

* 4/4 criteria
* 3/4 criteria
* 2/4 criteria
* 1/4 criteria
* 0/4 criteria

## Important caution for natural products

Lipinski rules should **not automatically be treated as exclusion criteria** in this project.

Natural products frequently fall outside conventional drug-like property ranges while still possessing biological activity.

Therefore, this analysis is used primarily to characterize the physicochemical properties of the candidates rather than automatically eliminate candidates.

Results are stored in:

`03_lipinski_analysis/`

---

# 7. PAINS Analysis

## Purpose

PAINS means **Pan-Assay Interference Structures**.

PAINS analysis identifies structural motifs that have historically been associated with potentially problematic assay behavior or nonspecific activity.

## Interpretation

The final candidates are divided into:

* PAINS-positive
* PAINS-negative

A PAINS-positive result does **not prove that the compound is inactive or a false positive**.

It indicates that the compound contains a structural pattern associated with potential assay-interference concerns.

Therefore, PAINS should be considered a **warning flag**, not definitive evidence against a candidate.

Results are stored in:

`04_pains_analysis/`

---

# 8. Morgan versus MACCS Comparison

## Purpose

This is particularly important because two different molecular fingerprint representations were used in the screening.

Morgan and MACCS capture molecular structural information differently.

The final candidates therefore provide an opportunity to examine how the two approaches contributed to the final candidate pool.

The final candidates can be divided into:

1. Morgan + MACCS
2. Morgan-only
3. MACCS-only

For each candidate, the analysis can examine:

* Morgan rank
* Morgan Active probability
* MACCS rank
* MACCS Active probability
* Mean Active probability
* Minimum Active probability

## Current result

The final candidate set contains:

* Morgan Top 50 = 50
* MACCS Top 50 = 50
* Shared candidates = 30
* Unique final candidates = 70

Therefore, the two fingerprint approaches showed substantial overlap.

## Interpretation

The overlap indicates that many molecules were consistently prioritized by both fingerprint-based ML approaches.

The Morgan-only and MACCS-only compounds are also important because they represent candidates identified by one representation but not the other.

This demonstrates why the UNION strategy was useful: it preserves candidates identified by either modeling approach rather than restricting the final list only to compounds predicted by both.

Results are stored in:

`05_morgan_maccs_comparison/`

---

# 9. Chemical Diversity Analysis

## Purpose

Chemical diversity analysis determines how structurally similar or different the 70 final candidates are.

Morgan fingerprints are used to calculate pairwise **Tanimoto similarity** between candidates.

The analysis provides:

* Pairwise similarity matrix
* Pairwise Tanimoto similarities
* Mean pairwise similarity
* Median pairwise similarity
* Maximum similarity
* Minimum similarity

## Interpretation

A high pairwise Tanimoto similarity indicates that two molecules are structurally similar.

A low similarity indicates greater structural dissimilarity.

The overall distribution helps determine whether the final candidate set contains:

* Many structurally similar compounds
* A mixture of related compounds
* Broad chemical diversity

## Important point

Chemical diversity should not be judged from a single similarity value alone.

The entire distribution and scaffold analysis should be considered together.

Results are stored in:

`06_chemical_diversity/`

---

# 10. Scaffold Analysis

## Purpose

Scaffold analysis identifies the major molecular frameworks represented among the final candidates.

Murcko scaffolds are calculated for the selected compounds.

The analysis provides:

* Unique scaffolds
* Scaffold frequency
* Number of candidates associated with each scaffold
* Individual candidate-to-scaffold mapping

## Interpretation

If many candidates share the same scaffold, the ML screening may be preferentially identifying one chemical family.

If many different scaffolds are present, the final candidate set represents broader structural diversity.

For experimental follow-up, scaffold diversity can be useful because selecting compounds from different scaffolds may provide broader chemical coverage.

Results are stored in:

`07_scaffold_analysis/`

---

# 11. Similarity to Known DPP4 Compounds

## Purpose

The COCONUT candidates can be compared with known DPP4 compounds from the original DPP4 activity dataset.

Morgan fingerprints and Tanimoto similarity are used to determine how structurally similar each COCONUT candidate is to known DPP4 compounds.

The analysis provides:

* Maximum similarity to known DPP4 compounds
* Mean similarity to known DPP4 compounds
* Nearest known DPP4 compound

## Interpretation

A candidate with relatively high similarity to a known DPP4-active compound may have stronger **chemical precedent** for DPP4-related activity.

A candidate with low similarity may represent a more chemically novel structure.

Both situations can be scientifically interesting.

### High similarity

This can provide supporting evidence based on chemical precedent.

### Low similarity

This can indicate potentially novel chemical space, although prediction confidence and applicability-domain considerations become particularly important.

## Important caution

Similarity to known DPP4 compounds does **not prove DPP4 activity**.

It should be interpreted as supporting chemical evidence alongside the ML predictions.

Results are stored in:

`08_similarity_to_dpp4_actives/`

---

# 12. Chemical-Space PCA

## Purpose

Principal Component Analysis (PCA) is used to visualize the chemical space occupied by:

* Known DPP4 compounds
* Final COCONUT candidates

Morgan fingerprints are converted into numerical representations and projected into two principal components.

## Interpretation

The PCA plot can show whether the COCONUT candidates:

* Overlap with known DPP4 chemical space
* Partially overlap with known compounds
* Occupy regions that are relatively distinct

## Scientific significance

Candidates located within or near the chemical space of known DPP4 compounds may have stronger chemical precedent.

Candidates occupying distinct regions may represent potentially novel structures.

However, PCA is a visualization method and does not itself establish biological activity.

The PCA results are stored in:

`09_chemical_space_analysis/`

---

# 13. How the Different Analyses Work Together

The analyses should not be interpreted independently.

A stronger interpretation comes from combining the evidence.

For example:

**Candidate A**

* High Morgan probability
* High MACCS probability
* Selected by both models
* Similar to known DPP4 compounds
* Structurally valid
* No PAINS alert
* Reasonable physicochemical properties

This would provide several independent pieces of supporting evidence.

In contrast:

**Candidate B**

* Selected only by one model
* Low similarity to known DPP4 compounds
* Outside the main chemical space
* PAINS-positive

This candidate would require greater caution, although it should not automatically be discarded solely on these characteristics.

---

# 14. What These Analyses Do NOT Prove

The post-screening analysis does not prove that any COCONUT compound is experimentally active against DPP4.

Machine-learning prediction provides computational prioritization.

Chemical similarity provides supporting structural evidence.

Physicochemical descriptors provide chemical characterization.

PAINS provides potential assay-interference warnings.

PCA provides chemical-space visualization.

None of these independently confirms biological activity.

Experimental validation or additional computational validation, such as molecular docking, would be required for stronger biological conclusions.

---

# 15. Recommended Candidate Prioritization

After completing the post-screening analyses, candidates can be prioritized using multiple pieces of evidence rather than a single arbitrary threshold.

Useful evidence includes:

1. Selection by both Morgan and MACCS
2. High predicted Active probability
3. Strong rank within the individual screening models
4. Structural similarity to known DPP4 compounds
5. Favorable chemical-property profile
6. Absence of PAINS alerts
7. Appropriate chemical diversity
8. Representation of interesting or diverse scaffolds
9. Position within or near the known DPP4 chemical space

This is a **post-screening prioritization step**, not a replacement for the original Top-50 UNION selection.

---

# 16. Recommended Next Stage

After post-screening analysis, the most promising candidates can be taken forward for additional computational investigation.

A possible workflow is:

COCONUT database
↓
Morgan screening
↓
Top 50
↓
MACCS screening
↓
Top 50
↓
UNION + canonical SMILES deduplication
↓
70 final unique candidates
↓
Post-screening characterization
↓
Chemical-property analysis
↓
Diversity and scaffold analysis
↓
Similarity to known DPP4 compounds
↓
Chemical-space analysis
↓
Candidate prioritization
↓
Molecular docking / structural evaluation
↓
Experimental validation

---

# 17. Current Screening Status

The current workflow successfully generated:

**70 final unique COCONUT candidates**

from:

**50 Morgan candidates + 50 MACCS candidates**

with:

**30 overlapping compounds**

The final candidate list was generated using the predefined UNION strategy and duplicate removal by canonical SMILES.

The post-screening analysis pipeline was then successfully completed.

All post-screening outputs are stored in:

`coconut_analysis/6_post_screening_analysis/`

---

# 18. Final Interpretation

The purpose of the post-screening stage is to answer three major questions:

### Question 1 — Are the candidates chemically valid and well characterized?

Answered through:

* Quality control
* Molecular descriptors
* Lipinski analysis
* PAINS analysis

### Question 2 — Are the candidates structurally diverse and chemically meaningful?

Answered through:

* Tanimoto similarity
* Chemical diversity analysis
* Scaffold analysis

### Question 3 — How relevant and novel are the candidates relative to known DPP4 chemistry?

Answered through:

* Morgan/MACCS comparison
* Similarity to known DPP4 compounds
* Chemical-space PCA

Together, these analyses provide a more complete characterization of the **70 ML-prioritized COCONUT candidates** before proceeding to downstream validation such as molecular docking or experimental testing.

---

# 19. Important Reporting Principle

When writing the manuscript, avoid describing the 70 compounds as "confirmed DPP4 inhibitors."

The appropriate terminology is:

* **predicted DPP4-active candidates**
* **ML-prioritized candidates**
* **putative DPP4 inhibitor candidates**
* **computationally prioritized COCONUT compounds**

The post-screening analyses provide additional evidence for prioritization, but biological activity remains to be experimentally validated.


# Post-Screening Results and Interpretation

The post-screening analysis was performed on the **70 final unique candidates** obtained by combining the Top 50 candidates from the Morgan- and MACCS-based screening approaches and removing duplicate molecules based on canonical SMILES.

## 1. Summary of Results

| Analysis                |            Result | Interpretation                                                            |
| ----------------------- | ----------------: | ------------------------------------------------------------------------- |
| Final candidates        |            **70** | Unique candidates retained after combining Morgan Top 50 and MACCS Top 50 |
| Valid RDKit structures  |  **70/70 (100%)** | All candidates were successfully recognized as valid molecular structures |
| Duplicate SMILES        |             **0** | No duplicate molecular structures were present in the final set           |
| Morgan + MACCS          |    **30 (42.9%)** | Candidates independently prioritized by both screening approaches         |
| Morgan-only             |    **20 (28.6%)** | Candidates selected only by the Morgan-based approach                     |
| MACCS-only              |    **20 (28.6%)** | Candidates selected only by the MACCS-based approach                      |
| Unique Murcko scaffolds |            **23** | The 70 candidates contain 23 distinct core structural frameworks          |
| Lipinski 4/4            | **67/70 (95.7%)** | 67 candidates satisfied all four evaluated Lipinski criteria              |
| PAINS positive          |     **0/70 (0%)** | None of the candidates triggered the applied PAINS structural alerts      |

---

## 2. Final Candidate Set

A total of **70 unique candidate molecules** were obtained from the screening workflow.

The final set was generated as:

**Morgan Top 50 + MACCS Top 50 − overlap**

There were 30 molecules common to both Top-50 lists:

$$
50 + 50 - 30 = 70
$$

Therefore, the final candidate set consists of **70 unique COCONUT natural-product molecules**.

These compounds represent the molecules prioritized by at least one of the two independent fingerprint-based ML screening approaches.

---

## 3. Structural Validity

All **70 of the 70 candidates (100%)** were successfully processed by RDKit.

No invalid molecular structures were detected.

This indicates that all selected molecules could be represented computationally as valid molecular structures and were therefore suitable for the subsequent descriptor calculation, Lipinski analysis, PAINS screening, fingerprint analysis, scaffold analysis, and chemical-space analysis.

**Interpretation:**

> The complete final candidate set passed the structural validity check, ensuring that subsequent computational analyses could be performed consistently across all 70 candidates.

---

## 4. Duplicate Structure Analysis

The final candidate set contained **0 duplicate canonical SMILES**.

This confirms that the final dataset contains **70 structurally unique molecules** after deduplication.

This is particularly important because the final candidate set was obtained by combining two screening approaches. The same molecule could be selected by both Morgan and MACCS, but it should appear only once in the final candidate library.

**Interpretation:**

> No duplicate molecular structures were present in the final candidate set, confirming that the 70 candidates represent unique molecules rather than repeated entries.

---

## 5. Morgan and MACCS Selection Agreement

The 70 candidates were divided according to their selection source:

* **30 compounds (42.9%)** were selected by both Morgan and MACCS.
* **20 compounds (28.6%)** were selected only by Morgan.
* **20 compounds (28.6%)** were selected only by MACCS.

Thus:

$$
30 + 20 + 20 = 70
$$

### Morgan + MACCS: 30 compounds

The 30 common candidates are particularly interesting because they were independently prioritized by **both fingerprint-based approaches**.

This agreement suggests that these molecules were identified as promising candidates despite the two approaches representing molecular structure differently.

However, this should **not** be interpreted as experimental confirmation of DPP4 activity.

Rather, these 30 molecules can be described as having **consensus computational prioritization**.

### Morgan-only: 20 compounds

These compounds were included in the Morgan Top 50 but not in the MACCS Top 50.

They provide additional candidates identified by the Morgan-based representation.

### MACCS-only: 20 compounds

These compounds were included in the MACCS Top 50 but not in the Morgan Top 50.

They provide additional candidates identified by the MACCS-based representation.

### Overall interpretation

The selection pattern demonstrates both **consensus and complementarity** between the two fingerprint approaches.

The 30 common molecules provide a consensus subset, whereas the 40 method-specific molecules expand the chemical coverage of the final candidate library.

---

## 6. Murcko Scaffold Analysis

The 70 final candidates contained **23 unique Murcko scaffolds**.

Murcko scaffold analysis identifies the core structural framework of molecules and provides an overview of scaffold-level chemical diversity.

The presence of:

$$
70\ \text{molecules} \rightarrow 23\ \text{unique scaffolds}
$$

indicates that the final candidate set contains multiple distinct structural frameworks rather than being composed entirely of closely related compounds.

However, the number of scaffolds alone does not fully describe the diversity of the dataset. The scaffold-frequency distribution should also be examined to determine whether a few scaffolds dominate the candidate set or whether the candidates are distributed relatively evenly across the 23 scaffolds.

**Interpretation:**

> The final candidate set represented 23 unique Murcko scaffolds, indicating the presence of multiple structural frameworks and providing evidence of scaffold-level chemical diversity.

---

## 7. Lipinski Rule-of-Five Analysis

A total of **67 out of 70 candidates (95.7%)** satisfied all four evaluated Lipinski criteria.

The four criteria used in this analysis were:

* Molecular weight ≤ 500 Da
* LogP ≤ 5
* Hydrogen-bond donors ≤ 5
* Hydrogen-bond acceptors ≤ 10

The remaining **3 compounds (4.3%)** did not satisfy all four criteria.

### Interpretation

The high proportion of Lipinski 4/4 candidates indicates that the majority of the computationally prioritized compounds have physicochemical characteristics that fall within the conventional Rule-of-Five ranges evaluated in this analysis.

This provides a favorable **preliminary drug-likeness profile** for the candidate set.

However, Lipinski compliance should not be interpreted as evidence that a compound:

* is an active DPP4 inhibitor,
* has good oral bioavailability,
* has favorable pharmacokinetics,
* is safe, or
* will show biological activity experimentally.

In addition, because the candidates are **natural products**, Lipinski violations should not automatically be considered grounds for removing a compound. Natural products can possess biological activity despite violating one or more Rule-of-Five criteria.

Therefore, the Lipinski analysis is best treated as a **descriptive post-screening characterization rather than a hard filtering criterion**.

---

## 8. PAINS Analysis

None of the 70 final candidates were identified as PAINS-positive.

Therefore:

$$
0/70 = 0\%
$$

triggered the applied PAINS structural alerts.

PAINS compounds contain structural patterns that can sometimes be associated with nonspecific or assay-interfering activity.

The absence of PAINS alerts in the current analysis is therefore a favorable result because none of the candidates showed the specific interference patterns recognized by the applied PAINS filter.

**Interpretation:**

> None of the 70 final candidates triggered the applied PAINS alerts, suggesting that the candidate set does not contain obvious PAINS structural patterns according to the implemented filter.

However, a PAINS-negative result does **not** prove that a compound is experimentally active, specific, or safe. It simply indicates that the compound did not match the structural alerts included in the applied PAINS filter.

---

# 9. Overall Interpretation

Taken together, the post-screening results provide a favorable preliminary computational profile for the 70 candidates.

The final candidate set:

* contains **70 unique molecules**;
* has **100% valid RDKit structures**;
* contains **no duplicate canonical SMILES**;
* includes **30 compounds independently prioritized by both Morgan and MACCS**;
* contains **23 unique Murcko scaffolds**, indicating multiple structural frameworks;
* has **67 compounds (95.7%) satisfying all four evaluated Lipinski criteria**; and
* contains **no PAINS-positive compounds** according to the applied filter.

These findings indicate that the final candidate library is structurally valid, contains multiple chemical scaffolds, and has a generally favorable preliminary physicochemical profile.

Importantly, these analyses **support candidate prioritization but do not establish biological activity**.

The 70 compounds should therefore be referred to as:

> **ML-prioritized putative DPP4 inhibitor candidates**

rather than confirmed DPP4 inhibitors.

---

# 10. Recommended Scientific Interpretation

A concise interpretation suitable for a manuscript or thesis would be:

> **Post-screening analysis identified 70 unique COCONUT natural-product candidates. All 70 compounds were successfully validated as RDKit-compatible molecular structures, with no duplicate canonical SMILES detected. Thirty compounds (42.9%) were independently prioritized by both Morgan- and MACCS-based screening approaches, while 20 compounds were uniquely selected by each approach, demonstrating both consensus and complementary candidate selection. The final candidates represented 23 unique Murcko scaffolds, indicating the presence of multiple structural frameworks. Furthermore, 67 compounds (95.7%) satisfied all four evaluated Lipinski Rule-of-Five criteria, while none of the candidates triggered the applied PAINS structural alerts. Collectively, these results indicate that the computationally prioritized candidate set possesses structural validity, scaffold diversity, and a generally favorable preliminary drug-likeness profile. These findings support further evaluation of the candidates but do not constitute experimental confirmation of DPP4 inhibitory activity.**

---

## 11. Important Next Analysis

The current results tell us that the **70 candidates are structurally and computationally reasonable**, but they do not yet tell us **which 70 are the strongest candidates**.

The most important next results to examine are:

1. **Similarity to known DPP4-active compounds**
2. **Morgan and MACCS active probabilities**
3. **Morgan/MACCS ranking of the 30 consensus molecules**
4. **Scaffold frequency**
5. **Molecular descriptor distributions**
6. **Chemical-space PCA**

These analyses will allow you to move from:

**"We obtained 70 computational candidates"**

to:

**"Here is why particular candidates within those 70 should be prioritized for further investigation."**
